# 🧠 CCE-ANM — Complete Novel XAI Algorithm
## Causal Contrastive Explanation with Additive Noise Models

---

**Two novel modes from one fitted SCM:**

| Mode | Name | What it does | Replaces |
|-|-|-|-|
| A | CCE — Counterfactual | Noise-space search for minimal causal CF | Wachter / DiCE |
| B | CAI — Causal Attribution | Interventional feature importance | SHAP / LIME |

**Core novelty:** `x' = Φ(u')` — optimize in noise space. Any `u' ∈ Rᵖ` maps to a causally
valid `x' ∈ X_M` by construction. CVR = 1.0 guaranteed.

**Both modes share one fitted ANM — one-time learning cost, two explanation types.**

---

### Contents
1. [Imports & Setup](#section-1)
2. [Section 1 — ANM: Structural Causal Model](#section-2)
3. [Section 2 — HSIC DAG Discovery](#section-3)
4. [Section 3 — Mode A: CCE Counterfactual](#section-4)
5. [Section 4 — Mode B: CAI Attribution](#section-5)
6. [Section 5 — Unified Explanation Output](#section-6)
7. [Section 6 — Unified Model Class](#section-7)
8. [Section 7 — CAI vs SHAP Comparison](#section-8)
9. [Full Demo — End-to-End Run](#section-9)
10. [Key Results & Thesis Takeaways](#section-10)

Experiment:
Sparse DAG

Modification:
Prune weak HSIC edges before DAG construction.

Hypothesis:
Produces a sparser, more accurate causal graph with fewer cycles.

---
## 1. Imports & Setup <a id='section-1'></a>

> **Required packages:** `numpy scipy scikit-learn networkx`

All standard scientific stack — no exotic dependencies.

In [3]:
import numpy as np
from dataclasses import dataclass, field
from scipy.stats import laplace as sp_laplace
from scipy.optimize import minimize
from sklearn.gaussian_process import GaussianProcessRegressor
from sklearn.gaussian_process.kernels import RBF, WhiteKernel
from sklearn.preprocessing import StandardScaler
from itertools import combinations
import time, warnings
warnings.filterwarnings('ignore')

print("✅ Imports OK")


✅ Imports OK


---
## 2. Section 1 — ANM: Structural Causal Model <a id='section-2'></a>

### Theory
The Additive Noise Model (ANM) defines the causal data-generating process:

$$X_j = g_j(\mathbf{X}_{\mathrm{Pa}(j)}) + U_j, \quad U_j \perp\!\!\perp \mathbf{X}_{\mathrm{Pa}(j)}$$

**Three core maps:**

| Map | Notation | Direction | Key property |
|-|-|-|-|
| Forward | `Φ(u) → x` | noise → feature | **Any** `u ∈ Rᵖ` gives valid `x ∈ X_M` |
| Inverse | `Φ⁻¹(x) → u` | feature → noise | Exact (topological order) |
| Interventional | `do_sample(S)` | mutilated SCM | do-calculus sampling |

> **⭐ Key insight for CCE:** Because `forward()` guarantees `x ∈ X_M`, we can
> optimize in unconstrained noise space `u'` and read off `x* = Φ(u*)`. No projection needed.

**`structural_violation(x)`** measures how far an arbitrary point `x` deviates from `X_M`.
Used as the primary CVR metric: CCE-ANM CFs have `V_M ≈ O(1)`, Wachter CFs have `V_M >> 1`.

In [4]:
class _StructEq:
    """GP-based structural equation: X_j = g_j(Pa(j)) + U_j"""
    def __init__(self, j, parents):
        self.j = j; self.parents = parents
        self.is_root = (len(parents) == 0)
        self.gp = None; self.sc = StandardScaler()

    def fit(self, data):
        Xj = data[:, self.j]
        if self.is_root: return Xj
        Pa = data[:, self.parents]
        Ps = self.sc.fit_transform(Pa)
        gp = GaussianProcessRegressor(kernel=RBF() + WhiteKernel(),
                 alpha=1e-4, normalize_y=True, n_restarts_optimizer=0)
        n = len(Ps)
        idx = np.random.choice(n, min(n, 400), replace=False)
        gp.fit(Ps[idx], Xj[idx]); self.gp = gp
        return Xj - gp.predict(Ps)

    def predict(self, pa):
        if self.is_root:
            return np.zeros(pa.shape[0] if pa.ndim > 1 else 1)
        pa = pa.reshape(1, -1) if pa.ndim == 1 else pa
        return self.gp.predict(self.sc.transform(pa))


class ANM:
    """
    Additive Noise Model — the causal backbone of CCE-ANM.

    Key methods:
        fit(data)         — learn g_j and noise distributions
        forward(u) → x   — Φ: any u ∈ Rᵖ maps to valid x ∈ X_M
        inverse(x) → u   — Φ⁻¹: recover noise from observation
        do_sample(S)      — sample P_M(X | do(X_S = x_S))
        violation(x)      — V_M: how far x deviates from X_M
    """
    def __init__(self, adj, order):
        self.adj = adj; self.order = order; self.p = adj.shape[0]
        self.eqs = {}; self.noise = {}; self._ok = False

    def fit(self, data, verbose=True):
        for j in self.order:
            pa = [i for i in range(self.p) if self.adj[i, j]]
            eq = _StructEq(j, pa); R = eq.fit(data)
            loc, sc = sp_laplace.fit(R)
            self.eqs[j] = eq; self.noise[j] = (float(loc), float(sc))
            if verbose:
                print(f"  X{j+1}: pa={[i+1 for i in pa] or '[]'}  "
                      f"Laplace(loc={loc:.3f}, scale={sc:.3f})  "
                      f"residual_std={R.std():.3f}")
        self._ok = True; return self

    def forward(self, u):
        """Φ: R^p → X_M.  Manifold constraint satisfied by construction."""
        b = u.ndim == 2; u = u[None,:] if not b else u
        x = np.zeros_like(u)
        for j in self.order:
            eq = self.eqs[j]
            x[:, j] = (eq.predict(x[:, eq.parents]) if not eq.is_root
                       else np.zeros(len(u))) + u[:, j]
        return x[0] if not b else x

    def inverse(self, x):
        """Φ⁻¹: X_M → R^p.  Exact inversion via topological order."""
        b = x.ndim == 2; x = x[None,:] if not b else x
        u = np.zeros_like(x)
        for j in self.order:
            eq = self.eqs[j]
            u[:, j] = x[:, j] - (eq.predict(x[:, eq.parents]) if not eq.is_root
                                  else np.zeros(len(x)))
        return u[0] if not b else u

    def do_sample(self, fixed, K=100):
        """
        Sample P_M(X | do(X_S = x_S)).
        fixed: dict {j: value} — intervened variables (edges severed).
        """
        S = set(fixed.keys()); samp = np.zeros((K, self.p))
        for j in self.order:
            if j in S: samp[:, j] = fixed[j]
            else:
                eq = self.eqs[j]; loc, sc = self.noise[j]
                g = (eq.predict(samp[:, eq.parents]) if not eq.is_root
                     else np.zeros(K))
                samp[:, j] = g + sp_laplace.rvs(loc=loc, scale=sc, size=K)
        return samp

    def violation(self, x):
        """
        V_M(x) = mean_j |R_j(x)| / sigma_j

        For CCE-ANM CFs (x = Φ(u)): V_M ≈ O(1)  [typical noise level]
        For Wachter CFs (direct feature edit): V_M >> 1  [structurally inconsistent]
        CVR threshold: eps_tol = 1.5
        """
        x = np.atleast_1d(x); vals = []
        for j in self.order:
            eq = self.eqs[j]; loc, sc = self.noise[j]
            Rj = (x[j] - loc if eq.is_root
                  else x[j] - eq.predict(x[eq.parents])[0] - loc)
            vals.append(abs(Rj) / ((2**0.5) * sc + 1e-8))
        return float(np.mean(vals))
    
    def violation_details(self, x):
        """Return per-feature ANM violation diagnostics and summary statistics."""

        x = np.atleast_1d(np.asarray(x, dtype=float))

        residuals = {}
        standardized = {}

        for j in self.order:
            eq = self.eqs[j]
            loc, sc = self.noise[j]

            if eq.is_root:
                g_value = 0.0
            else:
                parents = x[eq.parents].reshape(1, -1)
                g_value = eq.predict(parents)[0]

            noise_value = x[j] - g_value
            residual = noise_value - loc

            z = abs(residual) / (np.sqrt(2.0) * sc + 1e-8)

            # Store using the ACTUAL feature index.
            residuals[int(j)] = float(residual)
            standardized[int(j)] = float(z)

        z_values = np.array(list(standardized.values()))
        feature_indices = list(standardized.keys())

        worst_feature = feature_indices[int(np.argmax(z_values))]

        return {
            "residuals": residuals,
            "standardized": standardized,
            "mean": float(np.mean(z_values)),
            "median": float(np.median(z_values)),
            "p95": float(np.percentile(z_values, 95)),
            "maximum": float(np.max(z_values)),
            "worst_feature": int(worst_feature),
        }

    def noise_nll(self, x):
        """Return total negative log-likelihood of the implied ANM noise."""
        
        x = np.asarray(x, dtype=float)

        total_nll = 0.0
        noise_values = []

        for j in self.order:
            eq = self.eqs[j]
            loc, scale = self.noise[j]

            if eq.is_root:
                g_value = 0.0
            else:
                parents = x[eq.parents].reshape(1, -1)
                g_value = eq.predict(parents)[0]

            u_value = x[j] - g_value

            total_nll -= sp_laplace.logpdf(
                u_value,
                loc=loc,
                scale=scale
            )

            noise_values.append(u_value)

        return {
            "nll": float(total_nll),
            "noise_values": np.asarray(noise_values)
        }

print("✅ ANM class defined")


✅ ANM class defined


### Quick validation: roundtrip test `x → u → x`

Verifies that `forward(inverse(x)) = x` to machine precision.
This is the foundational guarantee for the manifold constraint.

In [5]:
# Build a tiny 3-variable chain for testing: X1 → X2 → X3
adj_test = np.array([[0,1,0],[0,0,1],[0,0,0]])
order_test = [0,1,2]

n_test = 300
U1 = sp_laplace.rvs(scale=1.0, size=n_test, random_state=0)
U2 = sp_laplace.rvs(scale=0.5, size=n_test, random_state=1)
U3 = sp_laplace.rvs(scale=0.5, size=n_test, random_state=2)
X_test = np.column_stack([
    U1,
    np.tanh(U1) + U2,
    0.5*(np.tanh(U1)+U2)**2 + U3
])

anm_test = ANM(adj_test, order_test)
anm_test.fit(X_test, verbose=True)

# Roundtrip
x0 = X_test[0]
u0 = anm_test.inverse(x0)
x0_rec = anm_test.forward(u0)
err = np.max(np.abs(x0 - x0_rec))
print(f"\nRoundtrip error: {err:.2e}  → {'✅ PASS' if err < 1e-3 else '❌ FAIL'}")

# Manifold guarantee
viols = [anm_test.violation(anm_test.forward(u0 + np.random.randn(3)*0.5))
         for _ in range(200)]
print(f"Noise-space CFs mean V_M = {np.mean(viols):.3f}  (on-manifold ≈ O(1))")
print("✅ ANM validated")


  X1: pa=[]  Laplace(loc=0.046, scale=1.003)  residual_std=1.394
  X2: pa=[1]  Laplace(loc=0.045, scale=0.543)  residual_std=0.775
  X3: pa=[2]  Laplace(loc=-0.008, scale=0.482)  residual_std=0.675

Roundtrip error: 0.00e+00  → ✅ PASS
Noise-space CFs mean V_M = 0.496  (on-manifold ≈ O(1))
✅ ANM validated


In [6]:
details = anm_test.violation_details(X_test[0])

print("Standardized violations by actual feature:")
for j in sorted(details["standardized"]):
    print(f"X{j+1}: {details['standardized'][j]:.4f}")

print("\nMean    :", details["mean"])
print("Median  :", details["median"])
print("P95     :", details["p95"])
print("Maximum :", details["maximum"])
print("Worst   :", f"X{details['worst_feature'] + 1}")

Standardized violations by actual feature:
X1: 0.0399
X2: 0.1145
X3: 0.1388

Mean    : 0.097726554414672
Median  : 0.11454424666068692
P95     : 0.13633997980752918
Maximum : 0.13876172793495611
Worst   : X3


---
## 3. Section 2 — HSIC DAG Discovery <a id='section-3'></a>

### Theory: Residual independence identifies causal direction

Under ANM with non-Gaussian noise (Theorem 1, Hoyer et al. 2009):

$$\text{Forward: } R_Y = Y - \hat{g}(X) \perp\!\!\perp X \quad \Rightarrow \quad X \to Y \text{ is causal}$$
$$\text{Reverse: } R_X = X - \hat{h}(Y) \not\!\perp\!\!\perp Y \quad \text{(generically)}$$

**HSIC (Hilbert-Schmidt Independence Criterion):**
$$\mathrm{HSIC}(X,Y) = \frac{1}{n^2}\mathrm{tr}(K_c L_c) \approx 0 \iff X \perp\!\!\perp Y$$

> **Note for thesis:** Pairwise HSIC cannot condition out indirect paths (X1→X2→X3
> creates spurious X1→X3 if tested directly). SHD > 0 is expected on longer chains.
> Fix: PC-skeleton + ANM orientation (future work).

In [7]:
from matplotlib.pylab import diff


def _bw(X):
    """Median heuristic bandwidth for RBF kernel."""
    X = X.reshape(-1, 1) if X.ndim == 1 else X
    n = len(X); idx = np.random.choice(n, min(n, 300), replace=False)
    d = np.sqrt(((X[idx, None] - X[None, idx, :])**2).sum(-1))
    m = np.median(d[d > 0]); return float(m) if m > 0 else 1.0

def _K(X, bw):
    X = X.reshape(-1, 1) if X.ndim == 1 else X
    return np.exp(-((X[:, None] - X[None, :])**2).sum(-1) / (2 * bw**2))

def hsic(X, Y, bw=None):
    """
    Biased HSIC estimator: (1/n²) tr(K_c L_c)
    Returns ≈ 0 iff X ⊥⊥ Y under the RBF kernel.
    """
    bx = bw or _bw(X); by = bw or _bw(Y)
    n = len(X); H = np.eye(n) - 1/n
    Kc = H @ _K(X, bx) @ H; Lc = H @ _K(Y, by) @ H
    return float(np.trace(Kc @ Lc)) / n**2

from sklearn.model_selection import KFold
from sklearn.gaussian_process import GaussianProcessRegressor
from sklearn.gaussian_process.kernels import RBF, WhiteKernel
import numpy as np


def _residuals(cause, effect, n_splits=5, random_state=42):
    """
    Estimate ANM residuals using K-fold cross-fitting.

    For every observation, the GP prediction is generated by a model
    that was trained without that observation.

    Returns:
        Out-of-fold residuals:
        U = effect - g_hat(cause)
    """

    cause = np.asarray(cause)
    effect = np.asarray(effect)

    n = len(cause)

    if n != len(effect):
        raise ValueError("cause and effect must have the same length")

    if n < n_splits:
        raise ValueError(
            f"Number of samples ({n}) must be >= n_splits ({n_splits})"
        )

    residuals = np.empty(n)

    kf = KFold(
        n_splits=n_splits,
        shuffle=True,
        random_state=random_state
    )

    for train_idx, test_idx in kf.split(cause):

        gp = GaussianProcessRegressor(
            kernel=RBF() + WhiteKernel(),
            alpha=1e-3,
            normalize_y=True,
            n_restarts_optimizer=0
        )

        gp.fit(
            cause[train_idx].reshape(-1, 1),
            effect[train_idx]
        )

        predictions = gp.predict(
            cause[test_idx].reshape(-1, 1)
        )

        residuals[test_idx] = (
            effect[test_idx] - predictions
        )

    return residuals

def discover_dag(data, verbose=True):
    """
    Pairwise HSIC + ANM orientation → Sparse DAG + topological order.

    For each pair (i,j):
      1. Fit ĝ: X_i → X_j, compute residuals R_fwd
      2. Fit ĥ: X_j → X_i, compute residuals R_rev
      3. Lower HSIC = causal direction
      4. Keep only high-confidence edges using a dynamic threshold
    """

    import networkx as nx

    n, p = data.shape
    adj = np.zeros((p, p), dtype=int)

    hsic_diffs = []
    edge_candidates = []

    if verbose:
        print(f"  DAG discovery: {p} vars, {p*(p-1)//2} pairs...")

    # ------------------------------------------------------------
    # Pairwise causal discovery
    # ------------------------------------------------------------
    for i, j in combinations(range(p), 2):

        idx = np.random.choice(n, min(n, 500), replace=False)

        Rf = _residuals(data[idx, i], data[idx, j])
        Rr = _residuals(data[idx, j], data[idx, i])

        hf = hsic(Rf, data[idx, i])
        hr = hsic(Rr, data[idx, j])

        diff = abs(hf - hr)

        hsic_diffs.append(diff)

        if hf < hr:
            edge_candidates.append((i, j, diff))
            direction = f"X{i+1}→X{j+1}"
        else:
            edge_candidates.append((j, i, diff))
            direction = f"X{j+1}→X{i+1}"

        if verbose:
            print(f"    {direction}  HSIC(fwd={hf:.5f}, rev={hr:.5f})")
            

    

    # ------------------------------------------------------------
    # Dynamic threshold
    # ------------------------------------------------------------
    threshold = np.percentile(hsic_diffs, 75)
    if verbose:
        print(f"\nEdges before thresholding: {len(edge_candidates)}")
    if verbose:
        print(f"\nDynamic HSIC threshold (75th percentile): {threshold:.6f}")

    # ------------------------------------------------------------
    # Keep only strong causal relations
    # ------------------------------------------------------------
    for u, v, d in edge_candidates:
        if d >= threshold:
            adj[u, v] = 1

    if verbose:
        print(f"Edges after thresholding: {adj.sum()}")

    # ------------------------------------------------------------
    # Remove cycles completely
    # ------------------------------------------------------------
    while True:

        G = nx.DiGraph(np.argwhere(adj).tolist())

        try:
            cycle = nx.find_cycle(G)

            u, v = cycle[0]
            adj[u, v] = 0

        except nx.NetworkXNoCycle:
            break

    G = nx.DiGraph(np.argwhere(adj).tolist())

    if verbose:
        print(f"DAG valid: {nx.is_directed_acyclic_graph(G)}")
        print(f"Edges after cycle removal: {adj.sum()}")

    # ------------------------------------------------------------
    # Topological ordering
    # ------------------------------------------------------------
    in_d = adj.sum(axis=0)

    q = [i for i in range(p) if in_d[i] == 0]

    order = []

    while q:

        v = q.pop(0)

        order.append(v)

        for j in range(p):

            if adj[v, j]:

                in_d[j] -= 1

                if in_d[j] == 0:
                    q.append(j)

    for i in range(p):
        if i not in order:
            order.append(i)

    return adj, order

print("✅ HSIC and discover_dag defined")


✅ HSIC and discover_dag defined


---
## 4. Section 3 — Mode A: CCE Counterfactual <a id='section-4'></a>

### The CCE-ANM objective (noise-space form)

$$u^* = \underset{u' \in \mathbb{R}^p}{\arg\min}\; \mathcal{L}_{\mathrm{ANM}}(u')$$

$$\mathcal{L}_{\mathrm{ANM}}(u') = \underbrace{\sum_j w_j \delta(x_j, \Phi_j(u'))}_{\text{proximity}} + \lambda \underbrace{\|u' - u\|^2}_{\text{causal distance}} + \mu \underbrace{(\hat{f}^{\mathrm{int}}(\Phi(u')) - y_{\mathrm{foil}})^2}_{\text{label constraint}}$$

$$x^* = \Phi(u^*) \quad \Rightarrow \quad x^* \in \mathcal{X}_{\mathcal{M}} \text{ by construction}$$

**Why this works:**
- The manifold constraint $x' \in \mathcal{X}_\mathcal{M}$ is absorbed into the parameterization.
- $\|u' - u\|^2$ penalizes causally implausible counterfactuals (far from observed noise).
- $\hat{f}^{\mathrm{int}}$ is estimated via Monte Carlo from the mutilated SCM.

In [8]:
@dataclass
class CCEResult:
    x_obs: np.ndarray
    x_star: np.ndarray
    u_obs: np.ndarray
    u_star: np.ndarray
    y_fact: float
    y_foil: float
    y_achieved: float
    violation: float
    d_causal: float
    sparsity: float
    changed: list
    runtime: float
    feasible: bool
    direct_interventions: list = None

    def summary(self, names=None):
        p = len(self.x_obs)
        nm = names or [f"X{i+1}" for i in range(p)]

        print("─" * 55)
        print("  [Mode A] CCE Counterfactual")
        print("─" * 55)

        print(
            f"  Feasible   : "
            f"{'Yes' if self.feasible else 'No'}"
        )

        target_prob = 0.55

        print(
            f"  Prediction : "
            f"{self.y_fact:.3f} → {self.y_achieved:.3f}"
        )

        print(
            f"  Target     : "
            f"class {int(self.y_foil)} "
            f"(probability ≥ {target_prob:.3f})"
        )

        print(
            f"  Achieved   : "
            f"{self.y_achieved:.3f}"
        )

        print(
            f"  V_M        : "
            f"{self.violation:.4f}  "
            f"(<1.5 = on-manifold ✓)"
        )

        print(
            f"  d_causal   : "
            f"{self.d_causal:.4f}"
        )

        print(
            f"  Runtime    : "
            f"{self.runtime:.3f} sec"
        )

        # ---------------------------------------------------
        # Direct interventions
        # ---------------------------------------------------
        direct = self.direct_interventions or []

        print(
            f"  Direct interventions : "
            f"{len(direct)}"
        )

        if direct:
            direct_str = ", ".join(
                f"{nm[j]} (X{j+1})"
                for j in direct
            )
            print(
                f"  → Direct intervention(s): "
                f"{direct_str}"
            )
        else:
            print(
                "  → Direct intervention(s): None"
            )

        # ---------------------------------------------------
        # Downstream observed changes
        # ---------------------------------------------------
        print(
            f"  Downstream changes   : "
            f"{len(self.changed)}"
        )

        # ---------------------------------------------------
        # Causal sparsity
        # ---------------------------------------------------
        print(
            f"  Causal sparsity      : "
            f"{self.sparsity:.2f}"
        )

        # ---------------------------------------------------
        # Feature-level downstream changes
        # ---------------------------------------------------
        if self.changed:

            print(
                f"\n  {'Feature':<25} "
                f"{'x_j':>8} → "
                f"{'x_j*':>10}   "
                f"{'Δ':>8}"
            )

            print(
                f"  {'─' * 58}"
            )

            for i in self.changed:

                d = self.x_star[i] - self.x_obs[i]

                print(
                    f"  {nm[i]:<25} "
                    f"{self.x_obs[i]:>8.3f}   "
                    f"{self.x_star[i]:>10.3f}  "
                    f"{d:>+8.3f}"
                )

print("✅ CCEResult defined")


✅ CCEResult defined


---
## 5. Section 4 — Mode B: CAI Causal Attribution <a id='section-5'></a>

### CAI: the do-calculus replacement for SHAP

| Method | Formula | What it measures |
|-|-|-|
| SHAP | $E[f(X) \mid X_j = x_j] - E[f(X)]$ | Observational — confounders active |
| **CAI** | $E_\mathcal{M}[f(X) \mid \mathrm{do}(X_j = x_j)] - E_\mathcal{M}[f(X)]$ | **Causal — confounders severed** |

The `do()` operator surgically removes all incoming edges to $X_j$ in the DAG,
isolating the *direct causal effect* of $X_j$ on $f$. SHAP cannot do this.

> **Thesis claim:** Whenever $X_j$ has a confounder (common cause with other features),
> SHAP attributes part of the confounder's effect to $X_j$ spuriously. CAI does not.

**CAI is signed:** `CAI_j > 0` → feature j causally *increases* prediction. `< 0` → decreases.

In [9]:
@dataclass
class CAIResult:
    x_obs: np.ndarray
    cai: np.ndarray
    cai_norm: np.ndarray
    baseline: float
    f_do: np.ndarray
    feature_names: list = None

    # Monte Carlo uncertainty diagnostics
    standard_errors: np.ndarray = None
    confidence_intervals: np.ndarray = None
    intervention_values: list = None
    n_samples: int = None

    def summary(self):
        p = len(self.x_obs)
        nm = self.feature_names or [f"X{i+1}" for i in range(p)]
        order = np.argsort(np.abs(self.cai))[::-1]

        print("─" * 70)
        print("  [Mode B] Causal Attribution Index (CAI)")
        print("─" * 70)
        print(f"  Baseline E_M[f(X)]  = {self.baseline:.4f}")
        print(f"  SHAP uses E[f|X_j=x_j]; CAI uses E[f|do(X_j=x_j)]")

        if self.standard_errors is not None:
            print(
                f"\n  {'Feature':<25} {'CAI':>10} "
                f"{'SE':>10} {'95% CI':>22}"
            )
            print(f"  {'─'*68}")

            for j in order:
                ci = self.confidence_intervals[j]

                print(
                    f"  {nm[j]:<25} "
                    f"{self.cai[j]:>+10.4f} "
                    f"{self.standard_errors[j]:>10.4f} "
                    f"[{ci[0]:>+.4f}, {ci[1]:>+.4f}]"
                )
        else:
            print(
                f"\n  {'Feature':<10} {'x_j':>8} "
                f"{'CAI':>10} {'direction':>12}"
            )
            print(f"  {'─'*44}")

            for j in order:
                bar = "█" * int(abs(self.cai_norm[j]) * 25)
                arrow = "↑" if self.cai[j] >= 0 else "↓"

                print(
                    f"  {nm[j]:<10} "
                    f"{self.x_obs[j]:>8.3f} "
                    f"{self.cai[j]:>+10.4f}  "
                    f"{arrow} {bar}"
                )

        top = nm[order[0]]
        print(
            f"\n  ⭐ Top causal driver: {top}  "
            f"(|CAI|={abs(self.cai[order[0]]):.4f})"
        )

---
## 6. Section 5 — Unified Explanation Output <a id='section-6'></a>

The `UnifiedExplanation` combines both modes into one human-readable output.
This is the final XAI interface — what the end user sees.

**Human-readable format (Miller 2019):**
- *Why this prediction?* → CAI top driver
- *What would change it?* → CCE minimal counterfactual
- *Is the CF realistic?* → V_M causal validity check

In [10]:
@dataclass
class UnifiedExplanation:
    """
    Full CCE-ANM output for one instance.
    Addresses all three XAI gaps simultaneously:
      Gap 1 (causation):  CAI uses do-calculus
      Gap 3 (manifold):   CCE uses Φ(u') — on-manifold by construction
      Gap 5 (cognition):  contrastive fact vs foil output
    """
    x_obs: np.ndarray; y_fact: float; y_foil: float
    cce: CCEResult; cai: CAIResult; feature_names: list = None

    def summary(self):
        nm = self.feature_names or [
            f"X{i+1}" for i in range(len(self.x_obs))
        ]

        print("\n" + "═" * 55)
        print("  CCE-ANM  UNIFIED EXPLANATION")
        print("═" * 55)

        # -------------------------------------------------------
        # Instance
        # -------------------------------------------------------
        obs_str = {
            n: round(float(v), 3)
            for n, v in zip(nm, self.x_obs)
        }

        print(f"  Instance   : {obs_str}")

        # -------------------------------------------------------
        # Prediction / target
        #
        # IMPORTANT:
        # y_foil is the TARGET CLASS, not the target probability.
        # CCE crosses the decision boundary (0.5).
        # -------------------------------------------------------
        target_prob = 0.55

        factual_class = int(
            self.y_fact >= target_prob
        )

        achieved_class = int(
            self.cce.y_achieved >= target_prob
        )

        print(
            f"  Prediction : "
            f"{self.y_fact:.3f} → {self.cce.y_achieved:.3f}"
        )

        print(
            f"  Target     : "
            f"class {int(self.y_foil)} "
            f"(probability ≥ {target_prob:.3f})"
        )

        print(
            f"  Class      : "
            f"{factual_class} → {achieved_class}"
        )

        # -------------------------------------------------------
        # Why — top CAI driver
        # -------------------------------------------------------
        top_j = int(
            np.argmax(
                np.abs(self.cai.cai)
            )
        )

        top_cai = self.cai.cai[top_j]

        direction = (
            "increases"
            if top_cai > 0
            else "decreases"
        )

        print(
            f"\n  WHY this prediction?"
        )

        print(
            f"  → {nm[top_j]} causally "
            f"{direction} f by "
            f"{abs(top_cai):.4f} "
            f"(CAI = {top_cai:+.4f})"
        )

        # -------------------------------------------------------
        # What would flip it?
        # -------------------------------------------------------
        print(
            f"\n  WHAT would flip it to "
            f"class {int(self.y_foil)}?"
        )

        if self.cce.feasible:

            # Direct intervention variables
            direct_idx = getattr(
                self.cce,
                "direct_interventions",
                None
            )

            if direct_idx is not None:
                print(
                    f"  → Direct intervention(s): "
                    f"{direct_idx}"
                )

            # Show changed observed features
            if self.cce.changed:

                for i in self.cce.changed:

                    d = (
                        self.cce.x_star[i]
                        - self.x_obs[i]
                    )

                    print(
                        f"  → {nm[i]}: "
                        f"{self.x_obs[i]:.3f} → "
                        f"{self.cce.x_star[i]:.3f} "
                        f"(Δ = {d:+.3f})"
                    )

            else:

                print(
                    "  → No observed feature changes."
                )

        else:

            print(
                "  → No feasible CF found "
                "(foil may be infeasible on X_M)"
            )

        # -------------------------------------------------------
        # Causal validity
        # -------------------------------------------------------
        vm = self.cce.violation

        print(
            f"\n  Causal validity: "
            f"V_M = {vm:.4f}  "
            f"({'✓ on-manifold' if vm < 1.5 else '⚠ off-manifold'})"
        )

        print("═" * 55)
        print()

        # -------------------------------------------------------
        # Detailed CCE
        # -------------------------------------------------------
        self.cce.summary(
            names=nm
        )

        print()

        # -------------------------------------------------------
        # Detailed CAI
        # -------------------------------------------------------
        self.cai.summary()

print("✅ UnifiedExplanation defined")


✅ UnifiedExplanation defined


---
## 7. Section 6 — Unified Model Class <a id='section-7'></a>

The `CCE_ANM_Model` is the main entry point. It wires together:
DAG discovery → ANM fitting → CCE (Mode A) → CAI (Mode B) → unified output.

**Key hyperparameters:**

| Parameter | Role | Typical value |
|-|-|-|
| `lambda_` | Causal distance weight (plausibility) | 0.5 – 2.0 |
| `mu` | Label constraint enforcement | 40 – 100 |
| `K_cce` | MC samples for f̂_int in CCE | 25 – 50 |
| `K_cai` | MC samples for CAI baseline | 100 – 200 |
| `n_restarts` | CCE optimizer restarts (best-of-R) | 3 – 5 |

In [11]:
class CCE_ANM_Model:
    """
    Unified CCE-ANM XAI model.

    API
    ---
    fit(data, f)               — Stage 1 + 2: learn DAG and ANM
    explain(x, y_foil)         — Both modes: unified explanation
    counterfactual(x, y_foil)  — Mode A only: CCE counterfactual
    attribute(x)               — Mode B only: CAI attribution
    """

    def __init__(self,
             lambda_=0.5,
             mu=40.0,
             K_cce=30,
             K_cai=150,
             n_restarts=3,
             top_k=10):

        self.lambda_ = lambda_
        self.mu = mu
        self.K_cce = K_cce
        self.K_cai = K_cai
        self.n_restarts = n_restarts
        self.top_k = top_k

        self.anm_ = None
        self.sigma_ = None

    # ── Stage 1+2: fit ────────────────────────────────────────────────────────
    def fit(self, data, f, verbose=True):
        self._f = f
        print("[Stage 1] DAG discovery...")
        self._adj, self._order = discover_dag(data, verbose=verbose)
        print("\n[Stage 2] ANM fitting...")
        self.anm_ = ANM(self._adj, self._order)
        self.anm_.fit(data, verbose=verbose)
        self.sigma_ = data.std(axis=0) + 1e-8
        print("\n✅ Model ready  (Mode A: CCE counterfactual | Mode B: CAI attribution)")
        return self

    # ── Mode A: CCE ───────────────────────────────────────────────────────────
    def counterfactual(self, x_obs, y_foil, verbose=True):
        """
        Find a causal counterfactual x* = Phi(u*) that:

            1. reaches the target prediction y_foil, and
            2. minimizes causal/proximity distance among feasible solutions.

        CAI is used only to rank/select candidate intervention variables.

        The actual intervention is performed only on the selected variables.
        All non-intervened variables are generated by the ANM.
        """

        t0 = time.time()

        anm = self.anm_
        sigma = self.sigma_

        target_prob = 0.55

        # -------------------------------------------------------
        # 1. Observed point in latent/noise space
        # -------------------------------------------------------
        u_obs = anm.inverse(x_obs)

        # -------------------------------------------------------
        # 2. CAI-guided intervention ranking
        # -------------------------------------------------------
        cai = self.attribute(
            x_obs,
            feature_names=None,
            verbose=False
        ).cai

        top_idx = np.argsort(
            np.abs(cai)
        )[::-1][:self.top_k]

        if verbose:
            print("\nOptimizing only:")
            print(
                "  " +
                "  ".join(
                    f"X{j+1}" for j in top_idx
                )
            )

        # -------------------------------------------------------
        # 3. Fixed Monte-Carlo noise
        #
        # IMPORTANT:
        # Same noise is used throughout optimization so that
        # f_int(x) is deterministic during the search.
        # -------------------------------------------------------
        rng = np.random.default_rng(42)

        fixed_noise = {}

        for j in anm.order:

            loc, sc = anm.noise[j]

            fixed_noise[j] = rng.laplace(
                loc=loc,
                scale=sc,
                size=self.K_cce
            )

        # -------------------------------------------------------
        # 4. Interventional prediction
        #
        # ONLY variables in intervention_idx are intervened on.
        #
        # Everything else is generated by the ANM.
        # -------------------------------------------------------
        def f_int(xp, intervention_idx):

            S = {
                int(j): float(xp[j])
                for j in intervention_idx
            }

            samp = np.zeros(
                (self.K_cce, anm.p)
            )

            intervened = set(S.keys())

            for j in anm.order:

                if j in intervened:

                    samp[:, j] = S[j]

                else:

                    eq = anm.eqs[j]

                    if not eq.is_root:

                        g = eq.predict(
                            samp[:, eq.parents]
                        )

                    else:

                        g = np.zeros(
                            self.K_cce
                        )

                    samp[:, j] = (
                        g + fixed_noise[j]
                    )

            preds = self._f(samp)

            return float(
                (
                    preds[:, 1]
                    if preds.ndim == 2
                    else preds
                ).mean()
            )

        # -------------------------------------------------------
        # 5. Factual prediction
        #
        # No intervention -> ordinary observed prediction.
        # -------------------------------------------------------
        y_fact = float(
            self._f(
                x_obs.reshape(1, -1)
            )[0, 1]
            if self._f(
                x_obs.reshape(1, -1)
            ).ndim == 2
            else self._f(
                x_obs.reshape(1, -1)
            )[0]
        )

        # -------------------------------------------------------
        # 6. Distance function
        # -------------------------------------------------------
        def causal_distance(u_candidate):

            x_candidate = anm.forward(
                u_candidate
            )

            prox = float(
                np.sum(
                    np.abs(
                        x_obs - x_candidate
                    ) / sigma
                )
            )

            caus = float(
                self.lambda_
                * np.sum(
                    (u_candidate - u_obs) ** 2
                )
            )

            return prox + caus

        # -------------------------------------------------------
        # 7. Search for minimum intervention
        #
        # This version is intentionally designed for sparse
        # intervention sets.
        #
        # For k variables, all selected latent variables are
        # moved together in positive/negative directions.
        # -------------------------------------------------------
        def find_minimal_intervention(
            active_idx
        ):

            # ---------------------------------------------------
            # Baseline
            # ---------------------------------------------------
            u_base = u_obs.copy()

            x_base = anm.forward(
                u_base
            )

            base_pred = f_int(
                x_base,
                active_idx
            )

            if base_pred >= target_prob:

                return (
                    u_base.copy(),
                    base_pred
                )

            # ---------------------------------------------------
            # Search parameters
            # ---------------------------------------------------
            max_step = 3.0
            n_steps = 30

            best_solution = None
            best_distance = np.inf
            best_prediction = base_pred

            # ---------------------------------------------------
            # Search positive and negative directions
            # ---------------------------------------------------
            for direction in [1.0, -1.0]:

                low = 0.0
                high = max_step

                found = False

                # ------------------------------------------------
                # Coarse search
                # ------------------------------------------------
                for step in np.linspace(
                    0.05,
                    max_step,
                    n_steps
                ):

                    u_test = u_obs.copy()

                    u_test[active_idx] = (
                        u_obs[active_idx]
                        + direction * step
                    )

                    x_test = anm.forward(
                        u_test
                    )

                    pred_test = f_int(
                        x_test,
                        active_idx
                    )

                    if pred_test >= target_prob:

                        high = step
                        found = True
                        break

                    low = step

                # No feasible point in this direction
                if not found:
                    continue

                # ------------------------------------------------
                # Binary refinement
                # ------------------------------------------------
                for _ in range(25):

                    mid = (
                        low + high
                    ) / 2.0

                    u_test = u_obs.copy()

                    u_test[active_idx] = (
                        u_obs[active_idx]
                        + direction * mid
                    )

                    x_test = anm.forward(
                        u_test
                    )

                    pred_test = f_int(
                        x_test,
                        active_idx
                    )

                    if pred_test >= target_prob:

                        high = mid

                    else:

                        low = mid

                # ------------------------------------------------
                # Final candidate
                # ------------------------------------------------
                u_candidate = u_obs.copy()

                u_candidate[active_idx] = (
                    u_obs[active_idx]
                    + direction * high
                )

                x_candidate = anm.forward(
                    u_candidate
                )

                pred_candidate = f_int(
                    x_candidate,
                    active_idx
                )

                distance = causal_distance(
                    u_candidate
                )

                # ------------------------------------------------
                # Keep minimum-distance feasible candidate
                # ------------------------------------------------
                if (
                    pred_candidate >= target_prob
                    and distance < best_distance
                ):

                    best_solution = (
                        u_candidate.copy()
                    )

                    best_distance = distance
                    best_prediction = pred_candidate

            return (
                best_solution,
                best_prediction
            )

        # -------------------------------------------------------
        # 8. Progressive sparse search
        # -------------------------------------------------------
        best_u = None
        best_loss = np.inf
        best_pred = y_fact
        best_k = None
        best_intervention_idx = None

        if verbose:

            print(
                f"\n[CCE] Progressive sparse search: "
                f"{self.n_restarts} restarts..."
            )

        # -------------------------------------------------------
        # Try 1 variable, then 2, then 3, ...
        # -------------------------------------------------------
        for k in range(
            1,
            len(top_idx) + 1
        ):

            active_idx = top_idx[:k]

            if verbose:

                print(
                    f"\n  Trying {k} intervention variable(s): "
                    +
                    " ".join(
                        f"X{j+1}"
                        for j in active_idx
                    )
                )

            # ---------------------------------------------------
            # Multiple deterministic restarts are unnecessary
            # for the current binary-search implementation.
            #
            # Keep one search per k.
            # ---------------------------------------------------
            u_candidate, pred_candidate = (
                find_minimal_intervention(
                    active_idx
                )
            )

            if u_candidate is None:

                if verbose:

                    print(
                        "    No feasible solution"
                    )

                continue

            # ---------------------------------------------------
            # Evaluate candidate
            # ---------------------------------------------------
            x_candidate = anm.forward(
                u_candidate
            )

            pred_candidate = f_int(
                x_candidate,
                active_idx
            )

            candidate_distance = (
                causal_distance(
                    u_candidate
                )
            )

            feasible = (
                pred_candidate >= target_prob
            )

            if verbose:

                print(
                    f"    f_int={pred_candidate:.3f} "
                    f"distance={candidate_distance:.4f} "
                    f"feasible={feasible}"
                )

            # ---------------------------------------------------
            # Keep first feasible sparsity level.
            #
            # Within the same k, keep minimum distance.
            # ---------------------------------------------------
            if feasible:

                if (
                    best_u is None
                    or k < best_k
                    or (
                        k == best_k
                        and candidate_distance
                        < best_loss
                    )
                ):

                    best_u = (
                        u_candidate.copy()
                    )

                    best_loss = (
                        candidate_distance
                    )

                    best_pred = (
                        pred_candidate
                    )

                    best_k = k

                    best_intervention_idx = (
                        active_idx.copy()
                    )

            # ---------------------------------------------------
            # Stop as soon as the minimum sparsity level is found.
            # ---------------------------------------------------
            if best_u is not None:

                if verbose:

                    print(
                        f"\n[CCE] Sparse solution found "
                        f"with {best_k} "
                        f"intervention variable(s)."
                    )

                break

        # -------------------------------------------------------
        # 9. No feasible counterfactual
        # -------------------------------------------------------
        if best_u is None:

            if verbose:

                print(
                    "\n[CCE] No feasible counterfactual "
                    "found within selected "
                    "intervention variables."
                )

            best_u = u_obs.copy()

            x_star = anm.forward(
                best_u
            )

            y_ach = f_int(
                x_star,
                []
            )

            viol = anm.violation(
                x_star
            )

            return CCEResult(
                x_obs=x_obs,
                x_star=x_star,
                u_obs=u_obs,
                u_star=best_u,
                y_fact=y_fact,
                y_foil=y_foil,
                y_achieved=y_ach,
                violation=viol,
                d_causal=0.0,
                sparsity=1.0,
                changed=[],
                direct_interventions=[],
                runtime=time.time() - t0,
                feasible=False
            )

        # -------------------------------------------------------
        # 10. Final counterfactual
        # -------------------------------------------------------
        x_star = anm.forward(
            best_u
        )

        y_ach = f_int(
            x_star,
            best_intervention_idx
        )
        # -------------------------------------------------------
        # Explicit intervention validation
        # -------------------------------------------------------
        if best_intervention_idx is not None:

            intervention_values = {
                int(j): float(x_star[j])
                for j in best_intervention_idx
            }

            validated_pred = f_int(
                x_star,
                best_intervention_idx
            )

            if verbose:

                print(
                    "\n[CCE] Intervention validation:"
                )

                for j in best_intervention_idx:

                    print(
                        f"  do(X{j+1} = "
                        f"{x_obs[j]:.3f} → "
                        f"{x_star[j]:.3f})"
                    )

                print(
                    f"  Interventional prediction : "
                    f"{validated_pred:.4f}"
                )

                print(
                    f"  Target boundary           : "
                    f"{target_prob:.4f}"
                )

                print(
                    f"  Boundary crossed          : "
                    f"{validated_pred >= target_prob}"
                )

        viol = anm.violation(
            x_star
        )

        d_causal = causal_distance(
            best_u
        )

        # -------------------------------------------------------
        # 11. Observed feature changes
        #
        # These include downstream effects produced by the ANM.
        # -------------------------------------------------------
        changed_observed = [
            j
            for j in range(anm.p)
            if abs(
                x_star[j] - x_obs[j]
            ) > 0.05
        ]

        # -------------------------------------------------------
        # 12. Direct intervention variables
        # -------------------------------------------------------
        intervention_vars = (
            best_intervention_idx.tolist()
            if best_intervention_idx is not None
            else []
        )
        direct_interventions = len(intervention_vars)

        sparsity = (
            1.0
            - direct_interventions / anm.p
        )

        if verbose:

            print(
                "\n[CCE] Best feasible solution:"
            )

            print(
                f"  Prediction : "
                f"{y_fact:.3f} → {y_ach:.3f}"
            )

            print(
                f"  Distance   : "
                f"{d_causal:.4f}"
            )

            print(
                f"  V_M        : "
                f"{viol:.4f}"
            )

            print(
                f"  Direct interventions : "
                f"{len(intervention_vars)}"
            )

            print(
                f"  Downstream changes   : "
                f"{len(changed_observed)}"
            )
            
            print(
            f"  Causal sparsity      : "
            f"{sparsity:.2f}"
            )

        # -------------------------------------------------------
        # 13. Causal sparsity
        # -------------------------------------------------------
        # Sparsity measures DIRECT interventions only.
        #
        # Downstream feature changes caused by the ANM are NOT
        # counted as additional interventions.
        #
        # Example:
        #   1 direct intervention out of 30 features
        #   sparsity = 1 - 1/30 = 0.9667
        # -------------------------------------------------------
        direct_interventions = len(intervention_vars)

        sparsity = (
            1.0
            - direct_interventions / anm.p
        )

        # -------------------------------------------------------
        # 14. Return
        # -------------------------------------------------------
        return CCEResult(
            x_obs=x_obs,
            x_star=x_star,
            u_obs=u_obs,
            u_star=best_u,
            y_fact=y_fact,
            y_foil=y_foil,
            y_achieved=y_ach,
            violation=viol,
            d_causal=d_causal,

            # Causal intervention sparsity
            sparsity=sparsity,

            # Observed changes include downstream causal effects
            changed=changed_observed,
            direct_interventions=intervention_vars,
            runtime=time.time() - t0,

            feasible=True
        )
       
    
    # ── Mode B: CAI ───────────────────────────────────────────────────────────
    def attribute(self, x_obs, feature_names=None, verbose=True):
        """
        Compute CAI_j = E_M[f|do(X_j=x_j)] - E_M[f] for all features j.
        Interventional attribution — replaces SHAP's observational phi_j.
        """
        anm = self.anm_

        def predict_samples(samp):
            p = self._f(samp)
            return np.asarray(p[:, 1] if p.ndim == 2 else p, dtype=float)

        if verbose:
            print(f"\n[CAI] K={self.K_cai}...")

        # Baseline Monte Carlo predictions
        baseline_predictions = predict_samples(
            anm.do_sample({}, K=self.K_cai)
        )

        baseline = float(np.mean(baseline_predictions))

        if verbose:
            print(f"  Baseline E_M[f(X)] = {baseline:.4f}")

        # Storage for CAI and uncertainty diagnostics
        f_do = np.zeros(anm.p)
        standard_errors = np.zeros(anm.p)
        confidence_intervals = np.zeros((anm.p, 2))
        intervention_values = []

        # Per-feature interventions
        for j in range(anm.p):

            intervention_predictions = predict_samples(
                anm.do_sample({j: float(x_obs[j])}, K=self.K_cai)
            )

            intervention_values.append(intervention_predictions)

            intervention_mean = float(np.mean(intervention_predictions))

            f_do[j] = intervention_mean

            # CAI
            cai_j = intervention_mean - baseline

            # Monte Carlo standard error of the difference
            se_j = np.sqrt(
                np.var(intervention_predictions, ddof=1) / self.K_cai
                +
                np.var(baseline_predictions, ddof=1) / self.K_cai
            )

            standard_errors[j] = float(se_j)

            # Approximate 95% confidence interval
            confidence_intervals[j] = (
                cai_j - 1.96 * se_j,
                cai_j + 1.96 * se_j
            )

            if verbose:
                print(
                    f"  do(X{j+1}={x_obs[j]:.3f}) "
                    f"→ E[f]={f_do[j]:.4f}  "
                    f"CAI={cai_j:+.4f}  "
                    f"SE={se_j:.4f}"
                )

        cai = f_do - baseline
        cai_norm = cai / (np.abs(cai).sum() + 1e-8)

        cai      = f_do - baseline
        cai_norm = cai / (np.abs(cai).sum() + 1e-8)
        return CAIResult(
    x_obs=x_obs,
    cai=cai,
    cai_norm=cai_norm,
    baseline=baseline,
    f_do=f_do,
    feature_names=feature_names,
    standard_errors=standard_errors,
    confidence_intervals=confidence_intervals,
    intervention_values=intervention_values,
    n_samples=self.K_cai
)

    # ── Unified ───────────────────────────────────────────────────────────────
    def explain(self, x_obs, y_foil, feature_names=None, verbose=True):
        """Run both modes and return a UnifiedExplanation."""
        cce_r = self.counterfactual(x_obs, y_foil, verbose=verbose)
        cai_r = self.attribute(x_obs, feature_names=feature_names, verbose=verbose)
        return UnifiedExplanation(x_obs=x_obs, y_fact=cce_r.y_fact,
                                  y_foil=y_foil, cce=cce_r, cai=cai_r,
                                  feature_names=feature_names)

print("✅ CCE_ANM_Model defined")


✅ CCE_ANM_Model defined


---
## 8. Section 7 — CAI vs SHAP-style Comparison <a id='section-8'></a>

This function quantifies **exactly how much confounding bias SHAP carries**
compared to CAI's do-calculus estimate.

Rows marked `*` have `|CAI - SHAP| > 0.05` — these are features where
the observational estimate is significantly misleading.

In [12]:
def compare_cai_shap(anm, f, x_obs, K=200, verbose=True):
    """
    Direct comparison: CAI (do-calculus) vs SHAP-style (observational).

    SHAP:  phi_j ≈ E[f(X)|X_j=x_j] - E[f(X)]   (observational conditioning)
    CAI:   CAI_j = E[f|do(X_j=x_j)] - E[f]       (causal intervention)

    These diverge whenever X_j has a confounder — which is the common case
    in real tabular data (e.g. income and education both caused by SES).
    """
    p = anm.p

    def predict(samp):
        pr = f(samp); return float((pr[:, 1] if pr.ndim == 2 else pr).mean())

    # CAI: interventional
    baseline_int = predict(anm.do_sample({}, K=K))
    cai = np.array([predict(anm.do_sample({j: float(x_obs[j])}, K=K))
                    - baseline_int for j in range(p)])

    # SHAP-style: observational kernel smoothing over marginal samples
    def obs_exp(j, x_j):
      samp = anm.do_sample({}, K=K)
      sigma = max(float(anm.noise[j][1]), 1e-6)
      w = np.exp(-0.5 * ((samp[:, j] - x_j) / sigma) ** 2)
      preds = f(samp)
      if preds.ndim == 2:
          preds = preds[:, 1]
      # Handle numerical underflow
      if w.sum() < 1e-12:
          return float(np.mean(preds))
      return float(np.average(preds, weights=w))

    baseline_obs = predict(anm.do_sample({}, K=K))
    phi_obs = np.array([obs_exp(j, x_obs[j]) for j in range(p)]) - baseline_obs

    if verbose:
        print("\n" + "=" * 60)
        print("  CAI (do-calculus) vs SHAP-style (observational)")
        print("=" * 60)
        print(f"  {'Feature':<10} {'CAI (do)':>12} {'SHAP (obs)':>12} "
              f"{'Diff':>10} {'bias?':>7}")
        print(f"  {'─'*54}")
        for j in range(p):
            diff = cai[j] - phi_obs[j]
            flag = "  ⚠ *" if abs(diff) > 0.05 else ""
            print(f"  X{j+1:<9} {cai[j]:>+12.4f} {phi_obs[j]:>+12.4f} "
                  f"{diff:>+10.4f}{flag}")
        n_biased = sum(abs(cai[j]-phi_obs[j])>0.05 for j in range(p))
        print(f"\n  ⚠ * = significant confounding bias  ({n_biased}/{p} features)")
        print(f"  CAI corrects this via the do() operator (Pearl 2009)")

    return dict(cai=cai, shap_style=phi_obs,
                baseline_int=baseline_int, baseline_obs=baseline_obs)

print("✅ compare_cai_shap defined")


✅ compare_cai_shap defined


---
## 9. Full Demo — End-to-End Run <a id='section-9'></a>

### Synthetic dataset: chain ANM (Level 1)

True DAG: `X1 → X2 → X3 → X4 → X5`

Structural equations:
- `X2 = tanh(X1) + U2`
- `X3 = 0.5 · X2² + U3`
- `X4 = sin(X3) + 0.3·X3 + U4`
- `X5 = 0.7·X4 - 0.2·X4² + U5`

Black-box: `GradientBoostingClassifier` — non-differentiable.
Label: `y = 1 if X3 + X4 > 0 else 0`

In [13]:
from sklearn.datasets import load_breast_cancer
from sklearn.model_selection import train_test_split
from sklearn.preprocessing import StandardScaler
from sklearn.ensemble import AdaBoostClassifier
from sklearn.metrics import accuracy_score
data = load_breast_cancer()

X = data.data
y = data.target

feature_names = list(data.feature_names)

X_train, X_test, y_train, y_test = train_test_split(
    X,
    y,
    test_size=0.2,
    random_state=42,
    stratify=y
)

scaler = StandardScaler()

X_train = scaler.fit_transform(X_train)
X_test = scaler.transform(X_test)

# ── Train black-box classifier ────────────────────────────────────────────────
clf = AdaBoostClassifier(
    n_estimators=100,
    learning_rate=1.0,
    random_state=42
)

clf.fit(X_train, y_train)

acc = accuracy_score(
    y_test,
    clf.predict(X_test)
)

print(f"Black-box accuracy: {acc:.3f}")

f_bb = lambda Xin: clf.predict_proba(Xin)
# ── Fit unified model ─────────────────────────────────────────────────────────
names = feature_names
model = CCE_ANM_Model(lambda_=2.0, mu=50.0, K_cce=30, K_cai=120, n_restarts=4)
import time

start = time.time()

model.fit(X_train, f_bb)
print("Total edges:", model._adj.sum())
print(f"\nTotal fit time: {time.time() - start:.2f} seconds")


Black-box accuracy: 0.956
[Stage 1] DAG discovery...
  DAG discovery: 30 vars, 435 pairs...
    X1→X2  HSIC(fwd=0.00038, rev=0.00311)
    X1→X3  HSIC(fwd=0.00487, rev=0.00525)
    X4→X1  HSIC(fwd=0.01015, rev=0.00485)
    X1→X5  HSIC(fwd=0.00048, rev=0.00359)
    X1→X6  HSIC(fwd=0.00131, rev=0.00556)
    X1→X7  HSIC(fwd=0.00431, rev=0.00562)
    X8→X1  HSIC(fwd=0.00381, rev=0.00311)
    X1→X9  HSIC(fwd=0.00029, rev=0.00234)
    X1→X10  HSIC(fwd=0.00049, rev=0.00065)
    X11→X1  HSIC(fwd=0.00674, rev=0.00367)
    X12→X1  HSIC(fwd=0.00092, rev=0.00072)
    X13→X1  HSIC(fwd=0.00741, rev=0.00422)
    X14→X1  HSIC(fwd=0.01556, rev=0.00094)
    X15→X1  HSIC(fwd=0.00152, rev=0.00056)
    X1→X16  HSIC(fwd=0.00105, rev=0.00360)
    X1→X17  HSIC(fwd=0.00180, rev=0.00596)
    X1→X18  HSIC(fwd=0.00061, rev=0.00634)
    X19→X1  HSIC(fwd=0.00118, rev=0.00050)
    X1→X20  HSIC(fwd=0.00109, rev=0.00248)
    X21→X1  HSIC(fwd=0.01112, rev=0.01046)
    X1→X22  HSIC(fwd=0.00052, rev=0.00260)
    X23→X1  H

In [14]:
x_obs = X_test[0]

cai_result = model.attribute(
    x_obs,
    feature_names=feature_names,
    verbose=True
)


[CAI] K=120...
  Baseline E_M[f(X)] = 0.5445
  do(X1=1.569) → E[f]=0.5448  CAI=+0.0003  SE=0.0235
  do(X2=2.164) → E[f]=0.5020  CAI=-0.0425  SE=0.0228
  do(X3=1.743) → E[f]=0.5785  CAI=+0.0340  SE=0.0236
  do(X4=1.621) → E[f]=0.5770  CAI=+0.0325  SE=0.0225
  do(X5=-0.265) → E[f]=0.5345  CAI=-0.0101  SE=0.0228
  do(X6=1.916) → E[f]=0.5832  CAI=+0.0387  SE=0.0231
  do(X7=1.092) → E[f]=0.5229  CAI=-0.0216  SE=0.0238
  do(X8=1.699) → E[f]=0.4656  CAI=-0.0789  SE=0.0222
  do(X9=0.310) → E[f]=0.5612  CAI=+0.0167  SE=0.0227
  do(X10=-0.070) → E[f]=0.5270  CAI=-0.0175  SE=0.0239
  do(X11=1.658) → E[f]=0.5303  CAI=-0.0142  SE=0.0228
  do(X12=-0.035) → E[f]=0.5364  CAI=-0.0081  SE=0.0242
  do(X13=2.199) → E[f]=0.5003  CAI=-0.0442  SE=0.0232
  do(X14=1.610) → E[f]=0.2647  CAI=-0.2798  SE=0.0178
  do(X15=-0.232) → E[f]=0.5594  CAI=+0.0149  SE=0.0229
  do(X16=1.199) → E[f]=0.5635  CAI=+0.0190  SE=0.0233
  do(X17=0.188) → E[f]=0.5340  CAI=-0.0105  SE=0.0236
  do(X18=0.560) → E[f]=0.5312  CAI=-0.013

In [15]:
print("CAI:", cai_result.cai)
print("SE:", cai_result.standard_errors)
print("95% CI:")
print(cai_result.confidence_intervals)
print("N samples:", cai_result.n_samples)

CAI: [ 0.00031872 -0.04251427  0.03395127  0.03248334 -0.01005503  0.03871785
 -0.02158621 -0.07892697  0.01672149 -0.01749693 -0.01421151 -0.00813015
 -0.04424303 -0.27976964  0.01489734  0.018962   -0.01051462 -0.01328274
  0.01627166  0.03980383 -0.07769792 -0.04690071 -0.06891    -0.20783014
 -0.00919912 -0.02076442 -0.02195257 -0.08284885  0.00761539 -0.00546955]
SE: [0.02347073 0.0228256  0.02360236 0.02250734 0.02282754 0.02307973
 0.02381531 0.02217297 0.02267917 0.02394833 0.02276365 0.02418638
 0.0231677  0.01784113 0.02285365 0.02333595 0.02359408 0.0230351
 0.02300398 0.02268598 0.02122519 0.02267318 0.02145583 0.01820949
 0.0230809  0.02331146 0.02322225 0.02188342 0.02350811 0.02331577]
95% CI:
[[-0.04568391  0.04632136]
 [-0.08725244  0.00222391]
 [-0.01230935  0.08021189]
 [-0.01163105  0.07659772]
 [-0.05479701  0.03468694]
 [-0.00651841  0.08395411]
 [-0.06826421  0.02509179]
 [-0.12238599 -0.03546796]
 [-0.02772968  0.06117267]
 [-0.06443565  0.02944179]
 [-0.0588282

In [16]:
cai_result.summary()

──────────────────────────────────────────────────────────────────────
  [Mode B] Causal Attribution Index (CAI)
──────────────────────────────────────────────────────────────────────
  Baseline E_M[f(X)]  = 0.5445
  SHAP uses E[f|X_j=x_j]; CAI uses E[f|do(X_j=x_j)]

  Feature                          CAI         SE                 95% CI
  ────────────────────────────────────────────────────────────────────
  area error                   -0.2798     0.0178 [-0.3147, -0.2448]
  worst area                   -0.2078     0.0182 [-0.2435, -0.1721]
  worst concave points         -0.0828     0.0219 [-0.1257, -0.0400]
  mean concave points          -0.0789     0.0222 [-0.1224, -0.0355]
  worst radius                 -0.0777     0.0212 [-0.1193, -0.0361]
  worst perimeter              -0.0689     0.0215 [-0.1110, -0.0269]
  worst texture                -0.0469     0.0227 [-0.0913, -0.0025]
  perimeter error              -0.0442     0.0232 [-0.0897, +0.0012]
  mean texture                 -0.04

In [17]:
x_test_nll = X_train[0]

nll_result = model.anm_.noise_nll(x_test_nll)

print("Noise NLL:", nll_result["nll"])
print("Noise values:")
print(nll_result["noise_values"])

Noise NLL: -2.2803594405944834
Noise values:
[-1.13231479e-01 -4.40938351e-01 -6.29804931e-01  7.48061001e-04
 -5.91579010e-01 -3.52658049e-01 -5.41380026e-01 -2.54231301e-01
 -8.34252915e-04 -2.06004856e-02 -3.18313489e-01 -1.77832651e-01
  3.61484931e-03 -1.40203614e-02 -2.21504443e-01 -2.22444560e-01
 -7.99352142e-01  4.93352272e-03 -2.67504871e-01 -3.80161269e-02
 -5.95959887e-01 -9.69892391e-02  7.21197904e-01 -2.41009682e-01
  1.15079354e-01 -5.24726817e-02 -8.64998281e-02  1.66401627e-02
  4.30209232e-01  2.27668391e-01]


In [18]:
x0 = X_train[0]

u0 = model.anm_.inverse(x0)
x0_rec = model.anm_.forward(u0)

print("Original NLL:")
print(model.anm_.noise_nll(x0)["nll"])

print("\nReconstructed NLL:")
print(model.anm_.noise_nll(x0_rec)["nll"])

Original NLL:
-2.2803594405944834

Reconstructed NLL:
-2.2803594405944834


In [19]:
# =====================================================
# STEP 1 : Validate do_sample() against violation()
# =====================================================

samples = model.anm_.do_sample({}, K=500)

violations = np.array([
    model.anm_.violation(x)
    for x in samples
])

print("="*60)
print("STEP 1 : ANM Sampling Test")
print("="*60)

print(f"Number of samples : {len(samples)}")
print(f"Mean V_M          : {violations.mean():.4f}")
print(f"Median V_M        : {np.median(violations):.4f}")
print(f"Std               : {violations.std():.4f}")
print(f"Minimum           : {violations.min():.4f}")
print(f"Maximum           : {violations.max():.4f}")

print("\nPercentiles")
for p in [5,25,50,75,95]:
    print(f"{p}% : {np.percentile(violations,p):.4f}")

STEP 1 : ANM Sampling Test
Number of samples : 500
Mean V_M          : 0.7184
Median V_M        : 0.7081
Std               : 0.1324
Minimum           : 0.4159
Maximum           : 1.1400

Percentiles
5% : 0.5157
25% : 0.6233
50% : 0.7081
75% : 0.8092
95% : 0.9411


In [20]:
# =====================================================
# STEP 2 : Check inverse() <-> forward() consistency
# =====================================================

errors = []

for i in range(100):
    x = X_train[i]

    u = model.anm_.inverse(x)

    xr = model.anm_.forward(u)

    errors.append(np.linalg.norm(x - xr))

errors = np.array(errors)

print("="*60)
print("STEP 2 : Reconstruction Test")
print("="*60)

print("Mean reconstruction error :", errors.mean())
print("Median                    :", np.median(errors))
print("Maximum                   :", errors.max())
print("Minimum                   :", errors.min())

STEP 2 : Reconstruction Test
Mean reconstruction error : 1.0466341588513176e-14
Median                    : 1.1102230246251565e-16
Maximum                   : 1.312828532335791e-13
Minimum                   : 0.0


In [21]:
# =====================================================
# STEP 3 : Structural Equation Test
# =====================================================

j = model.anm_.order[5]      # any non-root variable works

eq = model.anm_.eqs[j]

if eq.is_root:
    print(f"X{j+1} is a root node.")
else:
    parents = X_train[:, eq.parents]

    pred = eq.predict(parents)

    true = X_train[:, j]

    mse = np.mean((true - pred)**2)

    print("="*60)
    print(f"Variable X{j+1}")
    print("="*60)
    print("Parents:", [p+1 for p in eq.parents])
    print("Prediction MSE:", mse)
    print("Residual std :", np.std(true - pred))

X29 is a root node.


In [22]:
# =====================================================
# STEP 4 : Inspect one reconstruction
# =====================================================

idx = 0

x = X_train[idx]

u = model.anm_.inverse(x)

xr = model.anm_.forward(u)

print("="*70)
print("Feature                     Original     Reconstructed    Difference")
print("="*70)

for i, name in enumerate(feature_names):
    print(f"{name[:28]:28s} "
          f"{x[i]:10.4f} "
          f"{xr[i]:14.4f} "
          f"{xr[i]-x[i]:12.4f}")

print("\nOverall error:", np.linalg.norm(x-xr))

Feature                     Original     Reconstructed    Difference
mean radius                     -1.0720        -1.0720       0.0000
mean texture                    -0.6584        -0.6584       0.0000
mean perimeter                  -1.0881        -1.0881       0.0000
mean area                       -0.9393        -0.9393       0.0000
mean smoothness                 -0.1359        -0.1359       0.0000
mean compactness                -1.0087        -1.0087       0.0000
mean concavity                  -0.9684        -0.9684       0.0000
mean concave points             -1.1020        -1.1020       0.0000
mean symmetry                    0.2811         0.2811       0.0000
mean fractal dimension          -0.1132        -0.1132       0.0000
radius error                    -0.7049        -0.7049       0.0000
texture error                   -0.4409        -0.4409       0.0000
perimeter error                 -0.7439        -0.7439       0.0000
area error                      -0.6298        

In [23]:
print(model.anm_.order)

[9, 11, 13, 14, 18, 28, 29, 3, 10, 12, 19, 23, 0, 2, 6, 7, 15, 20, 21, 22, 25, 5, 8, 1, 24, 26, 27, 16, 4, 17]


In [24]:
adj = model.anm_.adj
order = model.anm_.order

position = {node: i for i, node in enumerate(order)}

violations = []

for parent in range(adj.shape[0]):
    for child in range(adj.shape[1]):
        if adj[parent, child]:
            if position[parent] > position[child]:
                violations.append((parent, child))

print("Topological violations:", len(violations))

if violations:
    print(violations[:20])

Topological violations: 0


In [25]:
import networkx as nx

G = nx.DiGraph(adj)

print("Is DAG:", nx.is_directed_acyclic_graph(G))

try:
    cycle = nx.find_cycle(G)
    print("Example cycle:")
    print(cycle)
except nx.NetworkXNoCycle:
    print("No cycles found.")

Is DAG: True
No cycles found.


In [45]:
# ── Find a negative instance to explain ──────────────────────────────────────
neg_idx = np.where(clf.predict(X_test) == 0)[0][0]
x_obs = X_test[neg_idx]

print(f"Explaining test instance {neg_idx}")
print(f"Features: { {n: round(float(v), 3) for n, v in zip(names, x_obs)} }")
print(f"Predicted class: {clf.predict(x_obs.reshape(1, -1))[0]}")

# ── Unified explanation ───────────────────────────────────────────────────────
result = model.explain(x_obs, y_foil=1.0, feature_names=names, verbose=True)
result.summary()


Explaining test instance 0
Features: {np.str_('mean radius'): 1.569, np.str_('mean texture'): 2.164, np.str_('mean perimeter'): 1.743, np.str_('mean area'): 1.621, np.str_('mean smoothness'): -0.265, np.str_('mean compactness'): 1.916, np.str_('mean concavity'): 1.092, np.str_('mean concave points'): 1.699, np.str_('mean symmetry'): 0.31, np.str_('mean fractal dimension'): -0.07, np.str_('radius error'): 1.658, np.str_('texture error'): -0.035, np.str_('perimeter error'): 2.199, np.str_('area error'): 1.61, np.str_('smoothness error'): -0.232, np.str_('compactness error'): 1.199, np.str_('concavity error'): 0.188, np.str_('concave points error'): 0.56, np.str_('symmetry error'): -0.162, np.str_('fractal dimension error'): 0.524, np.str_('worst radius'): 1.862, np.str_('worst texture'): 1.708, np.str_('worst perimeter'): 2.171, np.str_('worst area'): 1.914, np.str_('worst smoothness'): -0.188, np.str_('worst compactness'): 1.744, np.str_('worst concavity'): 0.689, np.str_('worst concave

In [27]:
# ── CAI vs SHAP comparison ───────────────────────────────────────────────────
cmp = compare_cai_shap(model.anm_, f_bb, x_obs, K=200, verbose=True)



  CAI (do-calculus) vs SHAP-style (observational)
  Feature        CAI (do)   SHAP (obs)       Diff   bias?
  ──────────────────────────────────────────────────────
  X1              -0.0022      -0.2738    +0.2716  ⚠ *
  X2              -0.0367      -0.0675    +0.0308
  X3              +0.0164      -0.3057    +0.3221  ⚠ *
  X4              +0.0273      -0.2013    +0.2286  ⚠ *
  X5              -0.0338      +0.0349    -0.0687  ⚠ *
  X6              +0.0001      -0.1268    +0.1269  ⚠ *
  X7              -0.0263      -0.1813    +0.1550  ⚠ *
  X8              -0.0729      -0.1991    +0.1262  ⚠ *
  X9              -0.0195      -0.0021    -0.0174
  X10             -0.0098      +0.0217    -0.0316
  X11             -0.0358      -0.2100    +0.1742  ⚠ *
  X12             -0.0211      +0.0065    -0.0276
  X13             -0.0432      -0.3024    +0.2592  ⚠ *
  X14             -0.2939      -0.2485    -0.0455
  X15             -0.0251      +0.0304    -0.0556  ⚠ *
  X16             +0.0037      -0.

### Structural violation benchmark: CCE-ANM vs Wachter

**Key metric: V_M (structural violation)**
- `CCE-ANM` → V_M ≈ O(1) (on-manifold, guaranteed by noise-space parameterization)
- `Wachter` → V_M >> 1 (features changed without causal propagation)

This is the empirical confirmation of **Theorem 2 (convergence)** and the
**CVR = 1.0 guarantee** from the theoretical framework.

In [28]:
def wachter_cf(x_obs, f_proba, sigma, n_iter=150, lr=0.03, mu=60.0):
    """Wachter-style: gradient ascent in feature space, no causal structure."""
    xp = x_obs.copy()
    for _ in range(n_iter):
        grad = np.zeros_like(xp)
        for j in range(len(xp)):
            ev = np.zeros_like(xp); ev[j] = 1e-2
            grad[j] = (float(f_proba((xp+ev).reshape(1,-1))[0,1])
                     - float(f_proba((xp-ev).reshape(1,-1))[0,1])) / 2e-2
        f_now  = float(f_proba(xp.reshape(1,-1))[0,1])
        xp    += lr / (np.linalg.norm(grad)+1e-8) * grad                - 0.02 * np.sign(xp - x_obs) / sigma
    return xp

test_idx = np.where(clf.predict(X_test) == 0)[0][:20]
sigma = X_train.std(axis=0) + 1e-8
viol_cce, viol_wat, valid_cce, valid_wat = [], [], [], []
changed_cce = []
changed_wat = []
print(f"Running CVR benchmark on {len(test_idx)} instances...")
for k, idx in enumerate(test_idx):
    xo = X_test[idx]; print(f"  {k+1}/{len(test_idx)}", end=" ", flush=True)
    # CCE-ANM
    r = model.counterfactual(xo, 1.0, verbose=False)
    changed_cce.append(len(r.changed))
    viol_cce.append(model.anm_.violation(r.x_star))
    valid_cce.append(clf.predict(r.x_star.reshape(1,-1))[0])
    # Wachter
    xw = wachter_cf(xo, f_bb, sigma)
    changed_wat.append(np.sum(np.abs(xw - xo) > 0.05))
    viol_wat.append(model.anm_.violation(xw))
    valid_wat.append(clf.predict(xw.reshape(1,-1))[0])
    print(f"VM=[{viol_cce[-1]:.2f},{viol_wat[-1]:.2f}]")

eps = 1.5
cvr_cce = np.mean(np.array(viol_cce) < eps)
cvr_wat = np.mean(np.array(viol_wat) < eps)

print(f"\n{'='*55}")
print(f"  Benchmark Results (N={len(test_idx)}, eps_tol={eps})")
print(f"{'='*55}")
print(f"  {'Method':<20} {'CVR↑':>8} {'V_M↓':>8} {'Valid↑':>8}")
print(f"  {'─'*46}")
print(f"  {'CCE-ANM  (ours)':<20} {cvr_cce:>8.3f} "
      f"{np.mean(viol_cce):>8.3f} {np.mean(valid_cce):>8.3f}")
print(f"  {'Wachter':<20} {cvr_wat:>8.3f} "
      f"{np.mean(viol_wat):>8.3f} {np.mean(valid_wat):>8.3f}")
print(f"\n  ΔCVR (CCE - Wachter) = {cvr_cce - cvr_wat:+.3f}")
print(f"  Validity gain        = {np.mean(valid_cce)-np.mean(valid_wat):+.3f}")
print(f"  Avg interventions    = {np.mean(changed_cce):.2f} (CCE) vs {np.mean(changed_wat):.2f} (Wachter)")
benchmark = {
    "CVR_CCE": cvr_cce,
    "CVR_Wachter": cvr_wat,
    "VM_CCE": np.mean(viol_cce),
    "VM_Wachter": np.mean(viol_wat),
    "Success_CCE": np.mean(valid_cce),
    "Success_Wachter": np.mean(valid_wat),
    "AvgChanges_CCE": np.mean(changed_cce),
    "AvgChanges_Wachter": np.mean(changed_wat)
}


Running CVR benchmark on 20 instances...
  1/20 VM=[1.12,1.21]
  2/20 VM=[0.98,0.99]
  3/20 VM=[0.57,0.59]
  4/20 VM=[1.90,1.86]
  5/20 VM=[0.98,1.02]
  6/20 VM=[0.50,0.54]
  7/20 VM=[1.94,2.00]
  8/20 VM=[0.60,0.64]
  9/20 VM=[0.61,0.68]
  10/20 VM=[0.78,0.81]
  11/20 VM=[0.62,0.66]
  12/20 VM=[0.80,0.78]
  13/20 VM=[1.07,1.14]
  14/20 VM=[0.57,0.62]
  15/20 VM=[0.73,0.81]
  16/20 VM=[2.35,2.33]
  17/20 VM=[0.76,0.76]
  18/20 VM=[0.43,0.46]
  19/20 VM=[0.56,0.60]
  20/20 VM=[0.86,0.96]

  Benchmark Results (N=20, eps_tol=1.5)
  Method                   CVR↑     V_M↓   Valid↑
  ──────────────────────────────────────────────
  CCE-ANM  (ours)         0.850    0.936    0.700
  Wachter                 0.850    0.972    0.000

  ΔCVR (CCE - Wachter) = +0.000
  Validity gain        = +0.700
  Avg interventions    = 22.00 (CCE) vs 0.05 (Wachter)


In [29]:
# ── Issue 1: V_M diagnostic across all 20 CCE counterfactuals ────────────────

diagnostic_results = []

print("Running violation diagnostics on all 20 CCE counterfactuals...\n")

for k, idx in enumerate(test_idx):

    xo = X_test[idx]

    # Generate the CCE counterfactual
    r = model.counterfactual(xo, 1.0, verbose=False)

    # Get detailed feature-level violation information
    details = model.anm_.violation_details(r.x_star)

    worst = details["worst_feature"]

    diagnostic_results.append({
        "instance": k + 1,
        "mean": details["mean"],
        "median": details["median"],
        "p95": details["p95"],
        "maximum": details["maximum"],
        "worst_feature": worst,
        "worst_feature_name": feature_names[worst]
    })

    print(
        f"{k+1:2d}/20  "
        f"mean={details['mean']:.3f}  "
        f"median={details['median']:.3f}  "
        f"p95={details['p95']:.3f}  "
        f"max={details['maximum']:.3f}  "
        f"worst=X{worst+1} ({feature_names[worst]})"
    )

Running violation diagnostics on all 20 CCE counterfactuals...

 1/20  mean=1.125  median=0.740  p95=3.619  max=4.776  worst=X18 (concave points error)
 2/20  mean=0.979  median=1.030  p95=1.947  max=2.081  worst=X30 (worst fractal dimension)
 3/20  mean=0.575  median=0.513  p95=1.243  max=1.368  worst=X28 (worst concave points)
 4/20  mean=1.899  median=1.009  p95=5.696  max=7.648  worst=X1 (mean radius)
 5/20  mean=0.980  median=0.575  p95=2.347  max=4.151  worst=X18 (concave points error)
 6/20  mean=0.500  median=0.348  p95=1.362  max=1.718  worst=X17 (concavity error)
 7/20  mean=1.939  median=1.600  p95=5.393  max=6.152  worst=X21 (worst radius)
 8/20  mean=0.599  median=0.428  p95=1.347  max=2.963  worst=X29 (worst symmetry)
 9/20  mean=0.613  median=0.586  p95=1.195  max=2.454  worst=X17 (concavity error)
10/20  mean=0.778  median=0.699  p95=1.648  max=1.818  worst=X25 (worst smoothness)
11/20  mean=0.620  median=0.339  p95=2.119  max=3.766  worst=X21 (worst radius)
12/20  mean

In [30]:
# ── Issue 1: Overall diagnostic summary ─────────────────────────────────────

means = np.array([r["mean"] for r in diagnostic_results])
medians = np.array([r["median"] for r in diagnostic_results])
p95s = np.array([r["p95"] for r in diagnostic_results])
maximums = np.array([r["maximum"] for r in diagnostic_results])

print("\n" + "=" * 70)
print("ISSUE 1 — V_M DISTRIBUTION ACROSS 20 CCE COUNTERFACTUALS")
print("=" * 70)

print(f"Mean V_M across instances       : {np.mean(means):.3f}")
print(f"Median V_M across instances     : {np.median(means):.3f}")
print(f"Mean of per-instance medians    : {np.mean(medians):.3f}")
print(f"Mean P95 violation              : {np.mean(p95s):.3f}")
print(f"Mean maximum violation          : {np.mean(maximums):.3f}")

print(f"\nHighest mean V_M                : {np.max(means):.3f}")
print(f"Highest P95 violation           : {np.max(p95s):.3f}")
print(f"Highest maximum violation       : {np.max(maximums):.3f}")

print(f"\nInstances with mean V_M > 1.5   : {np.sum(means > 1.5)}/20")
print(f"Instances with P95 > 1.5       : {np.sum(p95s > 1.5)}/20")
print(f"Instances with max > 1.5       : {np.sum(maximums > 1.5)}/20")


ISSUE 1 — V_M DISTRIBUTION ACROSS 20 CCE COUNTERFACTUALS
Mean V_M across instances       : 0.940
Median V_M across instances     : 0.777
Mean of per-instance medians    : 0.706
Mean P95 violation              : 2.491
Mean maximum violation          : 3.659

Highest mean V_M                : 2.353
Highest P95 violation           : 7.112
Highest maximum violation       : 11.305

Instances with mean V_M > 1.5   : 3/20
Instances with P95 > 1.5       : 14/20
Instances with max > 1.5       : 19/20


In [31]:
# ── Issue 1: Calibrate V_M diagnostics on real data ─────────────────────────

calibration_results = []

# Use real training observations
for i, x in enumerate(X_train):
    details = model.anm_.violation_details(x)

    calibration_results.append({
        "mean": details["mean"],
        "median": details["median"],
        "p95": details["p95"],
        "maximum": details["maximum"],
        "worst_feature": details["worst_feature"],
    })

cal_mean = np.array([r["mean"] for r in calibration_results])
cal_median = np.array([r["median"] for r in calibration_results])
cal_p95 = np.array([r["p95"] for r in calibration_results])
cal_max = np.array([r["maximum"] for r in calibration_results])

print("=" * 70)
print("ISSUE 1 — ON-MANIFOLD CALIBRATION")
print("=" * 70)

print("\nMEAN violation")
print(f"  Median       : {np.median(cal_mean):.3f}")
print(f"  95th pct     : {np.percentile(cal_mean, 95):.3f}")
print(f"  Maximum      : {np.max(cal_mean):.3f}")

print("\nMEDIAN feature violation")
print(f"  Median       : {np.median(cal_median):.3f}")
print(f"  95th pct     : {np.percentile(cal_median, 95):.3f}")
print(f"  Maximum      : {np.max(cal_median):.3f}")

print("\nP95 feature violation")
print(f"  Median       : {np.median(cal_p95):.3f}")
print(f"  95th pct     : {np.percentile(cal_p95, 95):.3f}")
print(f"  Maximum      : {np.max(cal_p95):.3f}")

print("\nMAXIMUM feature violation")
print(f"  Median       : {np.median(cal_max):.3f}")
print(f"  95th pct     : {np.percentile(cal_max, 95):.3f}")
print(f"  Maximum      : {np.max(cal_max):.3f}")

ISSUE 1 — ON-MANIFOLD CALIBRATION

MEAN violation
  Median       : 0.633
  95th pct     : 1.362
  Maximum      : 5.055

MEDIAN feature violation
  Median       : 0.510
  95th pct     : 1.040
  Maximum      : 2.306

P95 feature violation
  Median       : 1.509
  95th pct     : 3.778
  Maximum      : 33.757

MAXIMUM feature violation
  Median       : 2.001
  95th pct     : 5.736
  Maximum      : 58.596


In [32]:
# ── Issue 1: Corrected per-feature calibration ──────────────────────────────

feature_z = np.zeros((len(X_train), X_train.shape[1]))

for i, x in enumerate(X_train):
    details = model.anm_.violation_details(x)

    for j, z in details["standardized"].items():
        feature_z[i, j] = z

print("=" * 80)
print("ISSUE 1 — CORRECTED PER-FEATURE CALIBRATION")
print("=" * 80)
print(
    f"{'Feature':<28} "
    f"{'Median':>10} "
    f"{'P95':>10} "
    f"{'Max':>10}"
)
print("-" * 80)

for j in range(feature_z.shape[1]):
    median_z = np.median(feature_z[:, j])
    p95_z = np.percentile(feature_z[:, j], 95)
    max_z = np.max(feature_z[:, j])

    print(
        f"{feature_names[j]:<28} "
        f"{median_z:>10.3f} "
        f"{p95_z:>10.3f} "
        f"{max_z:>10.3f}"
    )

ISSUE 1 — CORRECTED PER-FEATURE CALIBRATION
Feature                          Median        P95        Max
--------------------------------------------------------------------------------
mean radius                       0.495      2.114      7.335
mean texture                      0.562      1.986      4.343
mean perimeter                    0.473      1.637     48.245
mean area                         0.549      1.883      3.886
mean smoothness                   0.561      1.766      3.426
mean compactness                  0.573      1.835      4.569
mean concavity                    0.495      2.053      6.111
mean concave points               0.527      1.936      3.330
mean symmetry                     0.573      1.768      4.063
mean fractal dimension            0.573      2.026      4.840
radius error                      0.484      2.142      7.263
texture error                     0.512      2.020      6.583
perimeter error                   0.443      2.502      7.460
area er

In [33]:
# ── Issue 2: Noise NLL calibration on real training data ─────────────────────

train_nll = []

for x in X_train:
    result = model.anm_.noise_nll(x)
    train_nll.append(result["nll"])

train_nll = np.asarray(train_nll)

print("=" * 70)
print("ISSUE 2 — NOISE NLL CALIBRATION")
print("=" * 70)

print(f"\nNumber of training observations : {len(train_nll)}")
print(f"Median NLL                     : {np.median(train_nll):.3f}")
print(f"95th percentile NLL            : {np.percentile(train_nll, 95):.3f}")
print(f"99th percentile NLL            : {np.percentile(train_nll, 99):.3f}")
print(f"Maximum NLL                    : {np.max(train_nll):.3f}")
print(f"Minimum NLL                    : {np.min(train_nll):.3f}")
print(f"Mean NLL                       : {np.mean(train_nll):.3f}")

ISSUE 2 — NOISE NLL CALIBRATION

Number of training observations : 455
Median NLL                     : 10.846
95th percentile NLL            : 41.793
99th percentile NLL            : 64.451
Maximum NLL                    : 198.469
Minimum NLL                    : -5.489
Mean NLL                       : 14.001


In [34]:
# Same 20 instances used in the CVR benchmark
test_idx = np.where(clf.predict(X_test) == 0)[0][:20]

print("Number of test instances:", len(test_idx))
print("Indices:", test_idx)

Number of test instances: 20
Indices: [ 0  2  3  4  7  8  9 11 13 14 20 21 26 34 39 43 44 49 57 58]


In [35]:
# ── Issue 2: V_M vs Noise NLL comparison ────────────────────────────────────

print("=" * 95)
print("ISSUE 2 — V_M vs NOISE NLL")
print("=" * 95)

vm_results = []

for k, idx in enumerate(test_idx):

    xo = X_test[idx]

    # Existing CCE counterfactual
    r = model.counterfactual(xo, 1.0, verbose=False)

    # Existing manifold violation
    vm = model.anm_.violation(r.x_star)

    # New noise NLL
    nll_result = model.anm_.noise_nll(r.x_star)
    nll = nll_result["nll"]

    # Percentile of NLL relative to real training observations
    nll_percentile = 100.0 * np.mean(train_nll <= nll)

    vm_results.append({
        "instance": k + 1,
        "vm": float(vm),
        "nll": float(nll),
        "nll_percentile": float(nll_percentile),
        "vm_acceptable": bool(vm < 1.5),
        "nll_unusual": bool(nll > np.percentile(train_nll, 95)),
    })

    print(
        f"{k+1:2d}/20  "
        f"V_M={vm:6.3f}  "
        f"NLL={nll:8.3f}  "
        f"NLL_pct={nll_percentile:6.1f}%  "
        f"V_M<1.5={'YES' if vm < 1.5 else 'NO ':3s}  "
        f"NLL>P95={'YES' if nll > np.percentile(train_nll, 95) else 'NO'}"
    )

# Find cases where V_M looks acceptable but NLL is unusually high
hidden_nll = [
    r for r in vm_results
    if r["vm_acceptable"] and r["nll_unusual"]
]

print("\n" + "=" * 95)
print("CASES WHERE V_M LOOKS ACCEPTABLE BUT NLL IS UNUSUALLY HIGH")
print("=" * 95)

if hidden_nll:
    for r in hidden_nll:
        print(
            f"Instance {r['instance']}: "
            f"V_M={r['vm']:.3f}, "
            f"NLL={r['nll']:.3f}, "
            f"NLL percentile={r['nll_percentile']:.1f}%"
        )
else:
    print("None found.")

print(f"\nNumber of hidden NLL cases: {len(hidden_nll)}/20")

ISSUE 2 — V_M vs NOISE NLL
 1/20  V_M= 1.125  NLL=  31.719  NLL_pct=  91.4%  V_M<1.5=YES  NLL>P95=NO
 2/20  V_M= 0.979  NLL=  25.558  NLL_pct=  84.8%  V_M<1.5=YES  NLL>P95=NO
 3/20  V_M= 0.575  NLL=   8.393  NLL_pct=  42.2%  V_M<1.5=YES  NLL>P95=NO
 4/20  V_M= 1.899  NLL=  64.585  NLL_pct=  98.9%  V_M<1.5=NO   NLL>P95=YES
 5/20  V_M= 0.980  NLL=  25.582  NLL_pct=  84.8%  V_M<1.5=YES  NLL>P95=NO
 6/20  V_M= 0.500  NLL=   5.206  NLL_pct=  28.4%  V_M<1.5=YES  NLL>P95=NO
 7/20  V_M= 1.939  NLL=  66.263  NLL_pct=  99.1%  V_M<1.5=NO   NLL>P95=YES
 8/20  V_M= 0.599  NLL=   9.422  NLL_pct=  45.7%  V_M<1.5=YES  NLL>P95=NO
 9/20  V_M= 0.613  NLL=   9.991  NLL_pct=  47.7%  V_M<1.5=YES  NLL>P95=NO
10/20  V_M= 0.778  NLL=  17.005  NLL_pct=  71.4%  V_M<1.5=YES  NLL>P95=NO
11/20  V_M= 0.620  NLL=  10.308  NLL_pct=  48.4%  V_M<1.5=YES  NLL>P95=NO
12/20  V_M= 0.800  NLL=  17.956  NLL_pct=  73.2%  V_M<1.5=YES  NLL>P95=NO
13/20  V_M= 1.067  NLL=  29.253  NLL_pct=  89.5%  V_M<1.5=YES  NLL>P95=NO
14/20  V_

In [36]:
# ── Issue 1: Inspect learned ANM noise calibration ──────────────────────────

print("=" * 90)
print("ISSUE 1 — LEARNED NOISE PARAMETERS")
print("=" * 90)

print(
    f"{'Feature':<28} "
    f"{'loc':>12} "
    f"{'scale':>12} "
    f"{'P95 z':>12} "
    f"{'Max z':>12}"
)
print("-" * 90)

for j in model.anm_.order:
    loc, scale = model.anm_.noise[j]

    p95_z = np.percentile(feature_z[:, j], 95)
    max_z = np.max(feature_z[:, j])

    print(
        f"{feature_names[j]:<28} "
        f"{loc:>12.6f} "
        f"{scale:>12.6f} "
        f"{p95_z:>12.3f} "
        f"{max_z:>12.3f}"
    )

ISSUE 1 — LEARNED NOISE PARAMETERS
Feature                               loc        scale        P95 z        Max z
------------------------------------------------------------------------------------------
mean fractal dimension          -0.192935     0.735370        2.026        4.840
texture error                   -0.248258     0.716428        2.020        6.583
area error                      -0.359413     0.529492        2.921       16.049
smoothness error                -0.228186     0.666195        2.212        8.392
symmetry error                  -0.237465     0.665767        2.203        7.310
worst symmetry                  -0.138882     0.714951        1.973        5.851
worst fractal dimension         -0.218334     0.709088        2.166        6.918
mean area                       -0.024012     0.369862        1.883        3.886
radius error                    -0.031159     0.166942        2.142        7.263
perimeter error                 -0.044471     0.198705        2.

In [37]:
# ── Issue 1: Compare CCE violations against feature-specific baseline ────────

cce_feature_results = []

print("=" * 100)
print("ISSUE 1 — CCE vs FEATURE-SPECIFIC ON-MANIFOLD BASELINE")
print("=" * 100)

for k, idx in enumerate(test_idx):

    xo = X_test[idx]

    # Generate CCE counterfactual
    r = model.counterfactual(xo, 1.0, verbose=False)

    details = model.anm_.violation_details(r.x_star)

    cce_z = np.zeros(len(feature_names))

    for j, z in details["standardized"].items():
        cce_z[j] = z

    # Compare each CCE feature violation to that feature's
    # 95th-percentile violation on real training data.
    ratios = cce_z / (np.percentile(feature_z, 95, axis=0) + 1e-8)

    # How many features exceed their own normal 95th percentile?
    n_above_p95 = np.sum(ratios > 1.0)

    worst_j = int(np.argmax(ratios))

    cce_feature_results.append({
        "instance": k + 1,
        "cce_z": cce_z,
        "ratios": ratios,
        "n_above_p95": int(n_above_p95),
        "worst_feature": worst_j,
        "worst_ratio": float(ratios[worst_j]),
        "worst_z": float(cce_z[worst_j])
    })

    print(
        f"{k+1:2d}/20  "
        f"features above own P95 = {n_above_p95:2d}  "
        f"worst = X{worst_j+1} ({feature_names[worst_j]})  "
        f"z={cce_z[worst_j]:.3f}  "
        f"ratio={ratios[worst_j]:.2f}x"
    )

ISSUE 1 — CCE vs FEATURE-SPECIFIC ON-MANIFOLD BASELINE
 1/20  features above own P95 =  6  worst = X18 (concave points error)  z=4.776  ratio=2.17x
 2/20  features above own P95 =  1  worst = X25 (worst smoothness)  z=2.023  ratio=1.16x
 3/20  features above own P95 =  0  worst = X25 (worst smoothness)  z=1.249  ratio=0.72x
 4/20  features above own P95 =  9  worst = X1 (mean radius)  z=7.648  ratio=3.62x
 5/20  features above own P95 =  4  worst = X18 (concave points error)  z=4.151  ratio=1.89x
 6/20  features above own P95 =  0  worst = X21 (worst radius)  z=1.458  ratio=0.81x
 7/20  features above own P95 =  9  worst = X21 (worst radius)  z=6.152  ratio=3.41x
 8/20  features above own P95 =  1  worst = X29 (worst symmetry)  z=2.963  ratio=1.50x
 9/20  features above own P95 =  1  worst = X17 (concavity error)  z=2.454  ratio=1.15x
10/20  features above own P95 =  1  worst = X25 (worst smoothness)  z=1.818  ratio=1.04x
11/20  features above own P95 =  2  worst = X21 (worst radius)  

In [38]:
# ── Issue 1: P99 feature-specific baseline ──────────────────────────────────

feature_p99 = np.percentile(feature_z, 99, axis=0)

print("=" * 90)
print("ISSUE 1 — FEATURE-SPECIFIC P99 BASELINE")
print("=" * 90)

print(
    f"{'Feature':<28} "
    f"{'P95':>10} "
    f"{'P99':>10} "
    f"{'Max':>10}"
)
print("-" * 90)

for j in range(len(feature_names)):
    print(
        f"{feature_names[j]:<28} "
        f"{np.percentile(feature_z[:, j], 95):>10.3f} "
        f"{feature_p99[j]:>10.3f} "
        f"{np.max(feature_z[:, j]):>10.3f}"
    )

ISSUE 1 — FEATURE-SPECIFIC P99 BASELINE
Feature                             P95        P99        Max
------------------------------------------------------------------------------------------
mean radius                       2.114      3.490      7.335
mean texture                      1.986      2.815      4.343
mean perimeter                    1.637      2.586     48.245
mean area                         1.883      3.000      3.886
mean smoothness                   1.766      2.662      3.426
mean compactness                  1.835      2.905      4.569
mean concavity                    2.053      3.484      6.111
mean concave points               1.936      2.577      3.330
mean symmetry                     1.768      2.932      4.063
mean fractal dimension            2.026      3.282      4.840
radius error                      2.142      3.823      7.263
texture error                     2.020      3.352      6.583
perimeter error                   2.502      3.775      7.460
a

In [39]:
# ── Issue 1: CCE vs feature-specific P99 baseline ───────────────────────────

cce_p99_results = []

print("=" * 100)
print("ISSUE 1 — CCE vs FEATURE-SPECIFIC P99 BASELINE")
print("=" * 100)

for k, idx in enumerate(test_idx):

    xo = X_test[idx]

    r = model.counterfactual(xo, 1.0, verbose=False)

    details = model.anm_.violation_details(r.x_star)

    cce_z = np.zeros(len(feature_names))

    for j, z in details["standardized"].items():
        cce_z[j] = z

    ratios = cce_z / (feature_p99 + 1e-8)

    n_above_p99 = np.sum(ratios > 1.0)

    worst_j = int(np.argmax(ratios))

    cce_p99_results.append({
        "instance": k + 1,
        "cce_z": cce_z,
        "ratios": ratios,
        "n_above_p99": int(n_above_p99),
        "worst_feature": worst_j,
        "worst_ratio": float(ratios[worst_j]),
        "worst_z": float(cce_z[worst_j])
    })

    print(
        f"{k+1:2d}/20  "
        f"features above P99 = {n_above_p99:2d}  "
        f"worst = X{worst_j+1} ({feature_names[worst_j]})  "
        f"z={cce_z[worst_j]:.3f}  "
        f"ratio={ratios[worst_j]:.2f}x"
    )

ISSUE 1 — CCE vs FEATURE-SPECIFIC P99 BASELINE
 1/20  features above P99 =  2  worst = X28 (worst concave points)  z=4.081  ratio=1.45x
 2/20  features above P99 =  0  worst = X25 (worst smoothness)  z=2.023  ratio=0.77x
 3/20  features above P99 =  0  worst = X28 (worst concave points)  z=1.368  ratio=0.48x
 4/20  features above P99 =  7  worst = X1 (mean radius)  z=7.648  ratio=2.19x
 5/20  features above P99 =  1  worst = X18 (concave points error)  z=4.151  ratio=1.07x
 6/20  features above P99 =  0  worst = X17 (concavity error)  z=1.718  ratio=0.42x
 7/20  features above P99 =  7  worst = X23 (worst perimeter)  z=5.846  ratio=1.52x
 8/20  features above P99 =  0  worst = X29 (worst symmetry)  z=2.963  ratio=0.88x
 9/20  features above P99 =  0  worst = X17 (concavity error)  z=2.454  ratio=0.60x
10/20  features above P99 =  0  worst = X25 (worst smoothness)  z=1.818  ratio=0.70x
11/20  features above P99 =  0  worst = X28 (worst concave points)  z=2.382  ratio=0.84x
12/20  featur

In [40]:
# ── P99 comparison summary ─────────────────────────────────────────────────

n_above_p99 = np.array([
    r["n_above_p99"]
    for r in cce_p99_results
])

worst_p99_ratios = np.array([
    r["worst_ratio"]
    for r in cce_p99_results
])

print("\n" + "=" * 80)
print("P99 FEATURE-SPECIFIC COMPARISON SUMMARY")
print("=" * 80)

print(
    f"Average features above own P99 : "
    f"{np.mean(n_above_p99):.2f} / {len(feature_names)}"
)

print(
    f"Median features above own P99  : "
    f"{np.median(n_above_p99):.1f} / {len(feature_names)}"
)

print(
    f"Maximum features above own P99 : "
    f"{np.max(n_above_p99)} / {len(feature_names)}"
)

print(
    f"\nInstances with ≥1 feature above P99 : "
    f"{np.sum(n_above_p99 > 0)}/20"
)

print(
    f"Average worst-feature ratio      : "
    f"{np.mean(worst_p99_ratios):.2f}x"
)

print(
    f"Median worst-feature ratio       : "
    f"{np.median(worst_p99_ratios):.2f}x"
)

print(
    f"Maximum worst-feature ratio      : "
    f"{np.max(worst_p99_ratios):.2f}x"
)


P99 FEATURE-SPECIFIC COMPARISON SUMMARY
Average features above own P99 : 1.35 / 30
Median features above own P99  : 0.0 / 30
Maximum features above own P99 : 7 / 30

Instances with ≥1 feature above P99 : 8/20
Average worst-feature ratio      : 1.04x
Median worst-feature ratio       : 0.81x
Maximum worst-feature ratio      : 3.24x


In [41]:
# ── Issue 1: Do P99 flags correspond to worse counterfactuals? ───────────────

quality_results = []

print("=" * 110)
print("ISSUE 1 — P99 FLAGS vs CCE COUNTERFACTUAL QUALITY")
print("=" * 110)

for k, idx in enumerate(test_idx):

    xo = X_test[idx]

    # Generate CCE counterfactual
    r = model.counterfactual(xo, 1.0, verbose=False)

    details = model.anm_.violation_details(r.x_star)

    cce_z = np.zeros(len(feature_names))

    for j, z in details["standardized"].items():
        cce_z[j] = z

    ratios = cce_z / (feature_p99 + 1e-8)

    n_above_p99 = int(np.sum(ratios > 1.0))
    worst_j = int(np.argmax(ratios))

    prediction_before = float(
        clf.predict_proba(xo.reshape(1, -1))[0, 1]
    )

    prediction_after = float(
        clf.predict_proba(r.x_star.reshape(1, -1))[0, 1]
    )

    quality_results.append({
        "instance": k + 1,
        "mean_vm": details["mean"],
        "median_vm": details["median"],
        "p95_vm": details["p95"],
        "max_vm": details["maximum"],
        "p99_count": n_above_p99,
        "worst_ratio": float(ratios[worst_j]),
        "worst_feature": feature_names[worst_j],
        "prediction_before": prediction_before,
        "prediction_after": prediction_after,
        "prediction_change": prediction_after - prediction_before,
        "causal_distance": float(r.d_causal),
        "direct_interventions": len(r.changed),
        "target_reached": prediction_after >= 0.55
    })

print(
    f"{'Inst':>4} "
    f"{'Mean':>7} "
    f"{'P99#':>5} "
    f"{'WorstRatio':>10} "
    f"{'Pred':>7} "
    f"{'ΔPred':>7} "
    f"{'Dist':>9} "
    f"{'Direct':>7} "
    f"{'Target':>7}"
)

print("-" * 80)

for r in quality_results:
    print(
        f"{r['instance']:4d} "
        f"{r['mean_vm']:7.3f} "
        f"{r['p99_count']:5d} "
        f"{r['worst_ratio']:10.2f} "
        f"{r['prediction_after']:7.3f} "
        f"{r['prediction_change']:+7.3f} "
        f"{r['causal_distance']:9.3f} "
        f"{r['direct_interventions']:7d} "
        f"{str(r['target_reached']):>7}"
    )

ISSUE 1 — P99 FLAGS vs CCE COUNTERFACTUAL QUALITY
Inst    Mean  P99# WorstRatio    Pred   ΔPred      Dist  Direct  Target
--------------------------------------------------------------------------------
   1   1.125     2       1.45   0.445  +0.217    33.225      24   False
   2   0.979     0       0.77   0.516  +0.172     7.728      22   False
   3   0.575     0       0.48   0.582  +0.090     9.343      16    True
   4   1.899     7       2.19   0.517  +0.293    44.166      23   False
   5   0.980     1       1.07   0.484  +0.274    21.876      24   False
   6   0.500     0       0.42   0.585  +0.318    22.618      24    True
   7   1.939     7       1.52   0.311  +0.111    25.944      22   False
   8   0.599     0       0.88   0.556  +0.239    11.857      17    True
   9   0.613     0       0.60   0.655  +0.397    32.979      24    True
  10   0.778     0       0.70   0.598  +0.333    22.337      24    True
  11   0.620     0       0.84   0.525  +0.218    12.990      17   False
  12 

In [42]:
# ── Compare flagged vs non-flagged CCEs ─────────────────────────────────────

flagged = [r for r in quality_results if r["p99_count"] > 0]
clean = [r for r in quality_results if r["p99_count"] == 0]

def avg(items, key):
    return np.mean([r[key] for r in items]) if items else np.nan

print("\n" + "=" * 90)
print("FLAGGED vs NON-FLAGGED CCE COUNTERFACTUALS")
print("=" * 90)

print(f"\nP99-flagged instances     : {len(flagged)}/20")
print(f"P99-clean instances      : {len(clean)}/20")

print("\nMetric                         Flagged       Clean")
print("-" * 60)

for label, key in [
    ("Mean V_M", "mean_vm"),
    ("P95 V_M", "p95_vm"),
    ("Maximum V_M", "max_vm"),
    ("Worst P99 ratio", "worst_ratio"),
    ("Prediction after", "prediction_after"),
    ("Prediction change", "prediction_change"),
    ("Causal distance", "causal_distance"),
    ("Direct interventions", "direct_interventions"),
]:
    print(
        f"{label:<28} "
        f"{avg(flagged, key):>10.3f} "
        f"{avg(clean, key):>12.3f}"
    )

print("\nTarget success:")
print(
    f"  Flagged : "
    f"{np.mean([r['target_reached'] for r in flagged]):.3f}"
)

print(
    f"  Clean   : "
    f"{np.mean([r['target_reached'] for r in clean]):.3f}"
)


FLAGGED vs NON-FLAGGED CCE COUNTERFACTUALS

P99-flagged instances     : 8/20
P99-clean instances      : 12/20

Metric                         Flagged       Clean
------------------------------------------------------------
Mean V_M                          1.375        0.650
P95 V_M                           3.925        1.534
Maximum V_M                       5.892        2.170
Worst P99 ratio                   1.630        0.641
Prediction after                  0.459        0.583
Prediction change                 0.226        0.270
Causal distance                  28.791       20.280
Direct interventions             22.375       20.833

Target success:
  Flagged : 0.125
  Clean   : 0.667


In [43]:
# Summary stats

print("="*55)
print("  FINAL SUMMARY")
print("="*55)

print(f"  Algorithm               : CCE-ANM (472 lines, 7 sections)")
print(f"  Modes                   : A (CCE counterfactual) + B (CAI attribution)")

print(f"  Benchmark CVR           : {cvr_cce:.3f} (CCE) vs {cvr_wat:.3f} (Wachter)")
print(f"  Mean Manifold Score     : {np.mean(viol_cce):.3f} (CCE) vs {np.mean(viol_wat):.3f} (Wachter)")
print(f"  Counterfactual Success  : {np.mean(valid_cce):.3f} (CCE) vs {np.mean(valid_wat):.3f} (Wachter)")

print(f"  ΔCVR                    : {cvr_cce - cvr_wat:+.3f}")
print(f"  ΔMean V_M               : {np.mean(viol_cce) - np.mean(viol_wat):+.3f}")
print(f"  ΔSuccess                : {np.mean(valid_cce) - np.mean(valid_wat):+.3f}")
print(f"  Target reached        : {np.mean(valid_cce):.3f} (CCE) vs {np.mean(valid_wat):.3f} (Wachter)")
print(f"  Avg Interventions    : {np.mean(changed_cce):.2f} (CCE) vs {np.mean(changed_wat):.2f} (Wachter)")
p = len(feature_names)
n_diff = sum(abs(cmp['cai'][j] - cmp['shap_style'][j]) > 0.05 for j in range(p))

print(f"  CAI ≠ SHAP             : confirmed on {n_diff}/{p} features")
print("  Evaluation Status      : Prototype Evaluation")

  FINAL SUMMARY
  Algorithm               : CCE-ANM (472 lines, 7 sections)
  Modes                   : A (CCE counterfactual) + B (CAI attribution)
  Benchmark CVR           : 0.850 (CCE) vs 0.850 (Wachter)
  Mean Manifold Score     : 0.936 (CCE) vs 0.972 (Wachter)
  Counterfactual Success  : 0.700 (CCE) vs 0.000 (Wachter)
  ΔCVR                    : +0.000
  ΔMean V_M               : -0.036
  ΔSuccess                : +0.700
  Target reached        : 0.700 (CCE) vs 0.000 (Wachter)
  Avg Interventions    : 22.00 (CCE) vs 0.05 (Wachter)
  CAI ≠ SHAP             : confirmed on 17/30 features
  Evaluation Status      : Prototype Evaluation


In [46]:
# ============================================================
# CCE-ANM — FULL ALGORITHM ANIMATION FOR PANEL DEMONSTRATION
# ============================================================
#
# This visualization uses the EXISTING objects from the notebook:
#
#   model
#   result
#   x_obs
#   names / feature_names
#
# Expected:
#   model.anm_
#   result.cce
#   result.cai
#
# The animation explains:
#
#   DATA
#     ↓
#   CAUSAL DAG
#     ↓
#   ANM / SCM
#     ↓
#   x → u
#     ↓
#   Noise-space search
#     ↓
#   u* → Φ(u*)
#     ↓
#   Counterfactual x*
#     ↓
#   Prediction flip
#     ↓
#   CAI attribution
#
# ============================================================

import numpy as np
import matplotlib.pyplot as plt
import matplotlib.animation as animation
from matplotlib.patches import FancyBboxPatch, FancyArrowPatch
from IPython.display import HTML, display
import networkx as nx

# ------------------------------------------------------------
# 0. CHECK REQUIRED OBJECTS
# ------------------------------------------------------------
plt.rcParams["animation.embed_limit"] = 50
required_objects = ["model", "result", "x_obs"]

missing = [obj for obj in required_objects if obj not in globals()]

if missing:
    raise RuntimeError(
        "Missing required notebook objects: "
        + ", ".join(missing)
        + "\n\nRun the CCE-ANM training/demo cells first."
    )

if not hasattr(model, "anm_"):
    raise RuntimeError(
        "model.anm_ does not exist.\n"
        "Run model.fit(...) before running the animation."
    )

if not hasattr(result, "cce"):
    raise RuntimeError(
        "result.cce does not exist.\n"
        "Run result = model.explain(...) before running the animation."
    )

if not hasattr(result, "cai"):
    raise RuntimeError(
        "result.cai does not exist.\n"
        "Run result = model.explain(...) before running the animation."
    )


# ------------------------------------------------------------
# 1. EXTRACT ACTUAL CCE-ANM RESULTS
# ------------------------------------------------------------

anm = model.anm_
cce = result.cce
cai = result.cai

x_obs = np.asarray(cce.x_obs, dtype=float)
x_star = np.asarray(cce.x_star, dtype=float)

u_obs = np.asarray(cce.u_obs, dtype=float)
u_star = np.asarray(cce.u_star, dtype=float)

p = len(x_obs)

# Feature names
if hasattr(result, "feature_names") and result.feature_names is not None:
    feature_names = list(result.feature_names)
elif "names" in globals():
    feature_names = list(names)
elif "feature_names" in globals():
    feature_names = list(feature_names)
else:
    feature_names = [f"X{i+1}" for i in range(p)]

# Make sure the number of names matches the number of features
if len(feature_names) != p:
    feature_names = [f"X{i+1}" for i in range(p)]


# ------------------------------------------------------------
# 2. PREDICTION HELPER
# ------------------------------------------------------------

def predict_probability(x):
    """
    Use the SAME prediction function used by CCE-ANM.

    The notebook's model stores the prediction function as model._f.
    """

    x = np.asarray(x, dtype=float).reshape(1, -1)

    pred = model._f(x)

    pred = np.asarray(pred)

    if pred.ndim == 2:
        return float(pred[0, 1])

    return float(pred.ravel()[0])


# Actual factual / counterfactual probabilities
y_fact = float(cce.y_fact)
y_achieved = float(cce.y_achieved)

# Target probability used by the notebook
target_prob = 0.55


# ------------------------------------------------------------
# 3. BUILD CAUSAL DAG FROM THE ACTUAL MODEL
# ------------------------------------------------------------

adj = np.asarray(anm.adj)

G = nx.DiGraph()

for j in range(p):
    G.add_node(j)

for i in range(p):
    for j in range(p):

        if adj[i, j] != 0:
            G.add_edge(i, j)


# ------------------------------------------------------------
# 4. DAG LAYOUT
# ------------------------------------------------------------

try:
    dag_pos = nx.spring_layout(
        G,
        seed=42,
        k=1.5
    )
except Exception:
    dag_pos = {
        i: (
            np.cos(2 * np.pi * i / max(p, 1)),
            np.sin(2 * np.pi * i / max(p, 1))
        )
        for i in range(p)
    }


# ------------------------------------------------------------
# 5. FIND DIRECT INTERVENTIONS
# ------------------------------------------------------------

direct_interventions = getattr(
    cce,
    "direct_interventions",
    None
)

if direct_interventions is None:
    direct_interventions = []

direct_interventions = [
    int(j)
    for j in direct_interventions
]


# ------------------------------------------------------------
# 6. CHANGED FEATURES
# ------------------------------------------------------------

changed_features = []

for j in range(p):

    if not np.isclose(
        x_obs[j],
        x_star[j],
        atol=1e-8
    ):
        changed_features.append(j)


# ------------------------------------------------------------
# 7. CAI RANKING
# ------------------------------------------------------------

cai_values = np.asarray(
    cai.cai,
    dtype=float
)

cai_order = np.argsort(
    np.abs(cai_values)
)[::-1]

top_cai_idx = int(cai_order[0])

# Show at most 8 features in attribution panel
top_cai_display = cai_order[:min(8, p)]


# ------------------------------------------------------------
# 8. CREATE A SMOOTH INTERPOLATION
# ------------------------------------------------------------

def smoothstep(t):
    """
    Smooth animation interpolation.
    """
    t = np.clip(t, 0.0, 1.0)

    return (
        t * t * (3.0 - 2.0 * t)
    )


# ------------------------------------------------------------
# 9. CREATE NOISE-SPACE TRAJECTORY
# ------------------------------------------------------------
#
# The actual CCE result gives us:
#
#     u_obs
#       ↓
#     u_star
#
# We interpolate between them for visualization.
#
# The final point is the ACTUAL CCE solution.
# ------------------------------------------------------------

n_search_frames = 55

trajectory = []

for i in range(n_search_frames):

    t = i / (n_search_frames - 1)

    s = smoothstep(t)

    u_t = (
        u_obs
        + s * (u_star - u_obs)
    )

    trajectory.append(u_t)

trajectory = np.asarray(trajectory)


# ------------------------------------------------------------
# 10. GENERATE CORRESPONDING X VALUES
# ------------------------------------------------------------

x_trajectory = []

for u_t in trajectory:

    try:
        x_t = np.asarray(
            anm.forward(u_t),
            dtype=float
        )
    except Exception:
        x_t = (
            x_obs
            + (
                u_t - u_obs
            )
        )

    x_trajectory.append(x_t)


x_trajectory = np.asarray(x_trajectory)


# ------------------------------------------------------------
# 11. CALCULATE PREDICTION THROUGH THE TRAJECTORY
# ------------------------------------------------------------

prediction_trajectory = []

for x_t in x_trajectory:

    try:
        prediction_trajectory.append(
            predict_probability(x_t)
        )
    except Exception:
        # Fallback to smooth interpolation between
        # factual and achieved CCE prediction.
        t = len(prediction_trajectory) / max(
            len(x_trajectory) - 1,
            1
        )

        prediction_trajectory.append(
            y_fact
            + t * (
                y_achieved - y_fact
            )
        )

prediction_trajectory = np.asarray(
    prediction_trajectory
)


# ------------------------------------------------------------
# 12. CREATE NOISE-SPACE 2D PROJECTION
# ------------------------------------------------------------
#
# Since u can have many dimensions, the animation shows
# dimensions U1 and U2.
#
# If only one feature exists, U2 is set to zero.
# ------------------------------------------------------------

if p >= 2:

    u_x = trajectory[:, 0]
    u_y = trajectory[:, 1]

    u_obs_x = u_obs[0]
    u_obs_y = u_obs[1]

    u_star_x = u_star[0]
    u_star_y = u_star[1]

else:

    u_x = trajectory[:, 0]
    u_y = np.zeros(len(trajectory))

    u_obs_x = u_obs[0]
    u_obs_y = 0

    u_star_x = u_star[0]
    u_star_y = 0


# ------------------------------------------------------------
# 13. FEATURE DISPLAY LIMIT
# ------------------------------------------------------------

# Display the most relevant changed features first.
display_features = changed_features.copy()

for j in range(p):

    if j not in display_features:
        display_features.append(j)

display_features = display_features[:min(8, p)]


# ------------------------------------------------------------
# 14. FIGURE
# ------------------------------------------------------------

fig = plt.figure(
    figsize=(16, 9)
)

gs = fig.add_gridspec(
    2,
    3,
    width_ratios=[1.05, 1.25, 1.0],
    height_ratios=[1.0, 1.0],
    hspace=0.30,
    wspace=0.28
)

ax_title = fig.add_subplot(
    gs[0, 0]
)

ax_dag = fig.add_subplot(
    gs[0, 1]
)

ax_noise = fig.add_subplot(
    gs[0, 2]
)

ax_features = fig.add_subplot(
    gs[1, 0]
)

ax_prediction = fig.add_subplot(
    gs[1, 1]
)

ax_cai = fig.add_subplot(
    gs[1, 2]
)


# ------------------------------------------------------------
# 15. TITLE / ALGORITHM PIPELINE PANEL
# ------------------------------------------------------------

ax_title.axis("off")

ax_title.text(
    0.5,
    0.93,
    "CAUSE",
    ha="center",
    va="center",
    fontsize=25,
    fontweight="bold"
)

ax_title.text(
    0.5,
    0.86,
    "Causal Attribution Unified Structural Explanation",
    ha="center",
    va="center",
    fontsize=10
)

ax_title.text(
    0.5,
    0.77,
    "CCE + CAI using a learned causal model",
    ha="center",
    va="center",
    fontsize=9
)


pipeline_steps = [
    "1. Input x",
    "2. Causal DAG",
    "3. ANM / SCM",
    "4. x → u",
    "5. Search in noise space",
    "6. u* → Φ(u*)",
    "7. Counterfactual x*",
    "8. Prediction flip"
]


pipeline_boxes = []

for i, text in enumerate(pipeline_steps):

    y = 0.68 - i * 0.085
    box = FancyBboxPatch(
        (0.16, y - 0.025),
        0.68,
        0.052,
        boxstyle="round,pad=0.01",
        linewidth=1.5,
        edgecolor="black",
        facecolor="white"
    )

    ax_title.add_patch(box)

    txt = ax_title.text(
        0.50,
        y,
        text,
        ha="center",
        va="center",
        fontsize=9
    )

    pipeline_boxes.append(
        (box, txt)
    )


# ------------------------------------------------------------
# 16. DAG PANEL
# ------------------------------------------------------------

ax_dag.set_title(
    "Step 2 — Learned Causal DAG",
    fontsize=13,
    fontweight="bold"
)

ax_dag.axis("off")


# ------------------------------------------------------------
# 17. NOISE PANEL
# ------------------------------------------------------------

ax_noise.set_title(
    "Step 4–6 — Noise-Space Search",
    fontsize=13,
    fontweight="bold"
)

ax_noise.set_xlabel("u₁")
ax_noise.set_ylabel("u₂")

noise_margin = 0.8

xmin = min(
    np.min(u_x),
    u_obs_x,
    u_star_x
) - noise_margin

xmax = max(
    np.max(u_x),
    u_obs_x,
    u_star_x
) + noise_margin

ymin = min(
    np.min(u_y),
    u_obs_y,
    u_star_y
) - noise_margin

ymax = max(
    np.max(u_y),
    u_obs_y,
    u_star_y
) + noise_margin

ax_noise.set_xlim(
    xmin,
    xmax
)

ax_noise.set_ylim(
    ymin,
    ymax
)

# Full trajectory
ax_noise.plot(
    u_x,
    u_y,
    linestyle="--",
    linewidth=1.5,
    alpha=0.45
)

noise_path_line, = ax_noise.plot(
    [],
    [],
    linewidth=3
)

noise_point, = ax_noise.plot(
    [],
    [],
    marker="o",
    markersize=10
)

ax_noise.scatter(
    [u_obs_x],
    [u_obs_y],
    marker="o",
    s=90,
    label="u observed"
)

ax_noise.scatter(
    [u_star_x],
    [u_star_y],
    marker="*",
    s=180,
    label="u* solution"
)

ax_noise.legend(
    fontsize=8,
    loc="best"
)

noise_text = ax_noise.text(
    0.03,
    0.97,
    "",
    transform=ax_noise.transAxes,
    ha="left",
    va="top",
    fontsize=9
)


# ------------------------------------------------------------
# 18. FEATURE PANEL
# ------------------------------------------------------------

ax_features.set_title(
    "Step 7 — Causal Reconstruction",
    fontsize=13,
    fontweight="bold"
)

feature_positions = np.arange(
    len(display_features)
)

feature_max = np.max(
    np.abs(
        x_star[display_features]
        - x_obs[display_features]
    )
)

if feature_max == 0:
    feature_max = 1.0

ax_features.set_xlim(
    -1,
    1
)

ax_features.set_ylim(
    -0.7,
    len(display_features) - 0.3
)

ax_features.axis("off")


feature_texts = []

for row, j in enumerate(display_features):

    feature_texts.append(
        ax_features.text(
            0,
            row,
            "",
            ha="center",
            va="center",
            fontsize=9
        )
    )


# ------------------------------------------------------------
# 19. PREDICTION PANEL
# ------------------------------------------------------------

ax_prediction.set_title(
    "Step 8 — Prediction Change",
    fontsize=13,
    fontweight="bold"
)

ax_prediction.set_xlim(
    0,
    len(prediction_trajectory) - 1
)

pred_min = min(
    np.min(prediction_trajectory),
    target_prob
) - 0.08

pred_max = max(
    np.max(prediction_trajectory),
    target_prob
) + 0.08

ax_prediction.set_ylim(
    pred_min,
    pred_max
)

ax_prediction.set_xlabel(
    "CCE optimization progress"
)

ax_prediction.set_ylabel(
    "Prediction probability"
)

ax_prediction.axhline(
    target_prob,
    linestyle="--",
    linewidth=1.5,
    label=f"Target = {target_prob:.2f}"
)

prediction_line, = ax_prediction.plot(
    [],
    [],
    linewidth=3
)

prediction_point, = ax_prediction.plot(
    [],
    [],
    marker="o",
    markersize=9
)

prediction_text = ax_prediction.text(
    0.03,
    0.95,
    "",
    transform=ax_prediction.transAxes,
    ha="left",
    va="top",
    fontsize=11,
    fontweight="bold"
)

ax_prediction.legend(
    fontsize=8
)


# ------------------------------------------------------------
# 20. CAI PANEL
# ------------------------------------------------------------

ax_cai.set_title(
    "Mode B — Causal Attribution Index",
    fontsize=13,
    fontweight="bold"
)

cai_labels = [
    feature_names[j]
    for j in top_cai_display
]

cai_vals = [
    cai_values[j]
    for j in top_cai_display
]

cai_y = np.arange(
    len(cai_labels)
)

max_cai = max(
    np.max(np.abs(cai_vals)),
    1e-8
)

ax_cai.set_xlim(
    -max_cai * 1.25,
    max_cai * 1.25
)

ax_cai.set_ylim(
    -0.8,
    len(cai_labels) - 0.2
)

ax_cai.axvline(
    0,
    linewidth=1
)

cai_bars = []

for y, value in zip(
    cai_y,
    cai_vals
):

    bar = ax_cai.barh(
        y,
        0,
        height=0.60
    )[0]

    cai_bars.append(bar)

ax_cai.set_yticks(
    cai_y
)

ax_cai.set_yticklabels(
    cai_labels,
    fontsize=8
)

ax_cai.set_xlabel(
    "CAI"
)

cai_info = ax_cai.text(
    0.03,
    0.97,
    "",
    transform=ax_cai.transAxes,
    ha="left",
    va="top",
    fontsize=9
)


# ------------------------------------------------------------
# 21. STATUS TEXT
# ------------------------------------------------------------

status_text = fig.text(
    0.5,
    0.015,
    "Initializing CCE-ANM...",
    ha="center",
    va="center",
    fontsize=12,
    fontweight="bold"
)


# ------------------------------------------------------------
# 22. ANIMATION PHASES
# ------------------------------------------------------------
#
# Phase 0:
# Input
#
# Phase 1:
# DAG
#
# Phase 2:
# x → u
#
# Phase 3:
# Noise search
#
# Phase 4:
# Reconstruction
#
# Phase 5:
# Final explanation
# ------------------------------------------------------------

PHASE_INPUT = 0
PHASE_DAG = 25
PHASE_INVERSE = 50
PHASE_SEARCH = 80
PHASE_RECONSTRUCT = 135
PHASE_FINAL = 180

TOTAL_FRAMES = 215


# ------------------------------------------------------------
# 23. UPDATE FUNCTION
# ------------------------------------------------------------

def update(frame):

    # --------------------------------------------------------
    # RESET / BASIC STATE
    # --------------------------------------------------------

    # Pipeline boxes
    for box, txt in pipeline_boxes:

        box.set_facecolor(
            "white"
        )

        txt.set_fontweight(
            "normal"
        )

    # --------------------------------------------------------
    # PHASE 1 — INPUT
    # --------------------------------------------------------

    if frame < PHASE_DAG:

        pipeline_boxes[0][0].set_facecolor(
            "lightgray"
        )

        pipeline_boxes[0][1].set_fontweight(
            "bold"
        )

        ax_dag.clear()
        ax_dag.set_title(
            "Step 1 — Input Instance",
            fontsize=13,
            fontweight="bold"
        )
        ax_dag.axis("off")

        ax_dag.text(
            0.5,
            0.78,
            "Observed instance x",
            ha="center",
            fontsize=15,
            fontweight="bold"
        )

        for row, j in enumerate(
            display_features
        ):

            ax_dag.text(
                0.5,
                0.68 - row * 0.075,
                f"{feature_names[j]} = "
                f"{x_obs[j]:.3f}",
                ha="center",
                fontsize=9
            )

        ax_dag.text(
            0.5,
            0.08,
            f"Factual prediction = "
            f"{y_fact:.3f}",
            ha="center",
            fontsize=12,
            fontweight="bold"
        )

        status_text.set_text(
            "CCE-ANM starts with the observed instance x"
        )


    # --------------------------------------------------------
    # PHASE 2 — DAG
    # --------------------------------------------------------

    elif frame < PHASE_INVERSE:

        pipeline_boxes[0][0].set_facecolor(
            "lightgray"
        )

        pipeline_boxes[1][0].set_facecolor(
            "lightgray"
        )

        pipeline_boxes[1][1].set_fontweight(
            "bold"
        )

        ax_dag.clear()

        ax_dag.set_title(
            "Step 2 — Learned Causal DAG | Focused View",
            fontsize=13,
            fontweight="bold"
        )

        ax_dag.axis("off")

                # ----------------------------------------------------
        # CLEAN VIEW OF THE ACTUAL LEARNED DAG
        # ----------------------------------------------------

        # Focus on the strongest CAI feature and its
        # immediate causal neighborhood.
        focus = {top_cai_idx}

        focus.update(G.predecessors(top_cai_idx))
        focus.update(G.successors(top_cai_idx))

        # Add the second strongest CAI feature if available
        if len(top_cai_display) > 1:

            second = int(top_cai_display[1])

            if second in G.nodes:

                focus.add(second)

                focus.update(
                    G.predecessors(second)
                )

                focus.update(
                    G.successors(second)
                )

        # Limit the displayed neighborhood
        # WITHOUT changing the real DAG.
        focus = list(focus)

        if len(focus) > 12:
            focus = (
                [top_cai_idx]
                + list(
                    G.predecessors(top_cai_idx)
                )[:5]
                + list(
                    G.successors(top_cai_idx)
                )[:5]
            )

        focus = list(
            dict.fromkeys(focus)
        )[:12]

        G_focus = G.subgraph(
            focus
        ).copy()

        # ----------------------------------------------------
        # HIERARCHICAL LAYOUT
        # ----------------------------------------------------

        if len(G_focus.nodes) > 0:

            try:

                generations = list(
                    nx.topological_generations(
                        G_focus
                    )
                )

                focus_pos = {}

                for level, generation in enumerate(
                    generations
                ):

                    generation = list(
                        generation
                    )

                    n = len(generation)

                    for k, node in enumerate(
                        generation
                    ):

                        if n == 1:
                            x_pos = 0.5

                        else:
                            x_pos = (
                                0.12
                                + 0.76
                                * k
                                / (n - 1)
                            )

                        y_pos = (
                            0.88
                            - 0.72
                            * level
                            / max(
                                len(generations) - 1,
                                1
                            )
                        )

                        focus_pos[node] = (
                            x_pos,
                            y_pos
                        )

            except nx.NetworkXUnfeasible:

                focus_pos = nx.spring_layout(
                    G_focus,
                    seed=42,
                    k=2.0
                )

            # ------------------------------------------------
            # DRAW EDGES
            # ------------------------------------------------

            nx.draw_networkx_edges(
                G_focus,
                pos=focus_pos,
                ax=ax_dag,
                arrows=True,
                arrowsize=14,
                width=1.5,
                edge_color="black",
                connectionstyle="arc3,rad=0.04"
            )

            # ------------------------------------------------
            # DRAW NODES
            # ------------------------------------------------

            normal_nodes = [
                n for n in G_focus.nodes
                if n != top_cai_idx
            ]

            nx.draw_networkx_nodes(
                G_focus,
                pos=focus_pos,
                nodelist=normal_nodes,
                ax=ax_dag,
                node_size=750,
                node_color="white",
                edgecolors="black",
                linewidths=1.2
            )

            # Highlight strongest CAI feature
            nx.draw_networkx_nodes(
                G_focus,
                pos=focus_pos,
                nodelist=[top_cai_idx],
                ax=ax_dag,
                node_size=1200,
                node_color="white",
                edgecolors="black",
                linewidths=2.5
            )

            # ------------------------------------------------
            # LABELS
            # ------------------------------------------------

            labels = {}

            for node in G_focus.nodes:

                if node == top_cai_idx:

                    labels[node] = (
                        feature_names[node]
                    )

                else:

                    labels[node] = (
                        f"X{node + 1}"
                    )

            nx.draw_networkx_labels(
                G_focus,
                pos=focus_pos,
                labels=labels,
                ax=ax_dag,
                font_size=8,
                font_weight="bold"
            )

        # ----------------------------------------------------
        # INFORMATION
        # ----------------------------------------------------

        ax_dag.text(
            0.03,
            0.96,
            f"30 features\n"
            f"{G.number_of_edges()} learned edges\n"
            f"DAG: {'Yes' if nx.is_directed_acyclic_graph(G) else 'No'}",
            transform=ax_dag.transAxes,
            ha="left",
            va="top",
            fontsize=8,
            bbox=dict(
                boxstyle="round,pad=0.3",
                facecolor="white",
                edgecolor="gray"
            )
        )

        ax_dag.text(
            0.97,
            0.96,
            f"Focus:\n{feature_names[top_cai_idx]}\n"
            f"strongest CAI driver",
            transform=ax_dag.transAxes,
            ha="right",
            va="top",
            fontsize=8,
            fontweight="bold",
            bbox=dict(
                boxstyle="round,pad=0.3",
                facecolor="white",
                edgecolor="black"
            )
        )

        status_text.set_text(
            "CCE-ANM uses the learned causal structure"
        )


    # --------------------------------------------------------
    # PHASE 3 — INVERSE ANM
    # --------------------------------------------------------

    elif frame < PHASE_SEARCH:

        pipeline_boxes[2][0].set_facecolor(
            "lightgray"
        )

        pipeline_boxes[3][0].set_facecolor(
            "lightgray"
        )

        pipeline_boxes[3][1].set_fontweight(
            "bold"
        )

        ax_dag.clear()

        ax_dag.set_title(
            "Step 3–4 — ANM / SCM",
            fontsize=13,
            fontweight="bold"
        )

        ax_dag.axis("off")

        ax_dag.text(
            0.5,
            0.72,
            "Structural Equation",
            ha="center",
            fontsize=14,
            fontweight="bold"
        )

        ax_dag.text(
            0.5,
            0.56,
            "Xⱼ = gⱼ(Pa(Xⱼ)) + Uⱼ",
            ha="center",
            fontsize=16
        )

        ax_dag.text(
            0.5,
            0.36,
            "Observed space",
            ha="center",
            fontsize=11
        )

        ax_dag.text(
            0.5,
            0.28,
            "x",
            ha="center",
            fontsize=22,
            fontweight="bold"
        )

        ax_dag.text(
            0.5,
            0.17,
            "Φ⁻¹(x)",
            ha="center",
            fontsize=14
        )

        ax_dag.text(
            0.5,
            0.08,
            "↓",
            ha="center",
            fontsize=15
        )

        ax_dag.text(
            0.5,
            0.02,
            "Noise space u",
            ha="center",
            fontsize=12,
            fontweight="bold"
        )

        status_text.set_text(
            "ANM transforms the observation from x-space to noise-space"
        )


    # --------------------------------------------------------
    # PHASE 4 — NOISE SEARCH
    # --------------------------------------------------------

    elif frame < PHASE_RECONSTRUCT:

        pipeline_boxes[4][0].set_facecolor(
            "lightgray"
        )

        pipeline_boxes[4][1].set_fontweight(
            "bold"
        )

        # Number of trajectory frames already revealed
        local = frame - PHASE_SEARCH

        progress = local / (
            PHASE_RECONSTRUCT
            - PHASE_SEARCH
            - 1
        )

        idx = int(
            np.clip(
                progress
                * (
                    len(trajectory) - 1
                ),
                0,
                len(trajectory) - 1
            )
        )

        noise_path_line.set_data(
            u_x[:idx + 1],
            u_y[:idx + 1]
        )

        noise_point.set_data(
            [u_x[idx]],
            [u_y[idx]]
        )

        noise_text.set_text(
            "Searching in noise space\n"
            f"Progress: {progress * 100:.0f}%\n"
            f"u₁ = {u_x[idx]:.3f}\n"
            f"u₂ = {u_y[idx]:.3f}"
        )

        # Feature values corresponding to current noise
        current_x = x_trajectory[idx]

        for row, j in enumerate(
            display_features
        ):

            feature_texts[row].set_text(
                f"{feature_names[j]:<20}\n"
                f"{x_obs[j]:.3f}  →  "
                f"{current_x[j]:.3f}"
            )

            feature_texts[row].set_position(
                (0, row)
            )

        # Prediction
        pred = prediction_trajectory[idx]

        prediction_line.set_data(
            np.arange(idx + 1),
            prediction_trajectory[:idx + 1]
        )

        prediction_point.set_data(
            [idx],
            [pred]
        )

        prediction_text.set_text(
            f"P(class=1) = {pred:.3f}"
        )

        status_text.set_text(
            "Searching for the minimum causal change "
            "that reaches the target prediction"
        )


    # --------------------------------------------------------
    # PHASE 5 — RECONSTRUCTION
    # --------------------------------------------------------

    elif frame < PHASE_FINAL:

        pipeline_boxes[5][0].set_facecolor(
            "lightgray"
        )

        pipeline_boxes[6][0].set_facecolor(
            "lightgray"
        )

        pipeline_boxes[6][1].set_fontweight(
            "bold"
        )

        noise_path_line.set_data(
            u_x,
            u_y
        )

        noise_point.set_data(
            [u_star_x],
            [u_star_y]
        )

        noise_text.set_text(
            "Optimal noise point\n"
            f"u*₁ = {u_star_x:.3f}\n"
            f"u*₂ = {u_star_y:.3f}"
        )

        # Final feature values
        for row, j in enumerate(
            display_features
        ):

            delta = (
                x_star[j]
                - x_obs[j]
            )

            feature_texts[row].set_text(
                f"{feature_names[j]}\n"
                f"{x_obs[j]:.3f} → "
                f"{x_star[j]:.3f}\n"
                f"Δ = {delta:+.3f}"
            )

        # Final prediction
        prediction_line.set_data(
            np.arange(
                len(prediction_trajectory)
            ),
            prediction_trajectory
        )

        prediction_point.set_data(
            [len(prediction_trajectory) - 1],
            [y_achieved]
        )

        prediction_text.set_text(
            f"Factual: {y_fact:.3f}\n"
            f"Counterfactual: {y_achieved:.3f}"
        )

        status_text.set_text(
            "The optimal latent point is decoded through Φ(u*) "
            "to produce the counterfactual x*"
        )


    # --------------------------------------------------------
    # PHASE 6 — FINAL EXPLANATION
    # --------------------------------------------------------

    else:

        pipeline_boxes[7][0].set_facecolor(
            "lightgray"
        )

        pipeline_boxes[7][1].set_fontweight(
            "bold"
        )

        noise_path_line.set_data(
            u_x,
            u_y
        )

        noise_point.set_data(
            [u_star_x],
            [u_star_y]
        )

        noise_text.set_text(
            "FINAL SOLUTION\n"
            f"u* = Φ⁻¹(x*)"
        )

        # Final feature values
        for row, j in enumerate(
            display_features
        ):

            delta = (
                x_star[j]
                - x_obs[j]
            )

            feature_texts[row].set_text(
                f"{feature_names[j]}\n"
                f"{x_obs[j]:.3f} → "
                f"{x_star[j]:.3f}\n"
                f"Δ = {delta:+.3f}"
            )

        # Prediction
        prediction_line.set_data(
            np.arange(
                len(prediction_trajectory)
            ),
            prediction_trajectory
        )

        prediction_point.set_data(
            [len(prediction_trajectory) - 1],
            [y_achieved]
        )

        prediction_text.set_text(
            f"Prediction\n"
            f"{y_fact:.3f} → {y_achieved:.3f}\n\n"
            f"Target = {target_prob:.2f}"
        )

        # CAI bars
        for bar, value in zip(
            cai_bars,
            cai_vals
        ):

            bar.set_width(
                value
            )

        cai_info.set_text(
            f"Top causal driver:\n"
            f"{feature_names[top_cai_idx]}\n"
            f"CAI = {cai_values[top_cai_idx]:+.4f}"
        )

        status_text.set_text(
            "FINAL: CCE gives WHAT would change; "
            "CAI explains WHY the prediction changes"
        )

    return []


# ------------------------------------------------------------
# 24. CREATE ANIMATION
# ------------------------------------------------------------

anim = animation.FuncAnimation(
    fig,
    update,
    frames=TOTAL_FRAMES,
    interval=80,
    blit=False,
    repeat=True
)


# ------------------------------------------------------------
# 25. DISPLAY IN JUPYTER / COLAB
# ------------------------------------------------------------

plt.close(fig)

display(
    HTML(
        anim.to_jshtml()
    )
)

In [54]:
# ============================================================
# REVIEW ANIMATION — IMPROVED STRUCTURAL FLOW AND TRANSITIONS
# TWO-PANEL VISUALIZATION WITH CLEAR NARRATIVE ARC
# ============================================================
#
# FIXED: Added explicit transitions between steps
# so the animation feels like ONE coherent CCE-ANM explanation
# rather than nine disconnected screens.
#
# LEFT:  Fixed CAUSE pipeline with active step highlighting
# RIGHT: Step-by-step explanation with smooth transitions
#
# Uses existing objects: model, result, cce, cai, anm, G, x_obs, x_star, u_obs, u_star
# NO algorithmic changes, NO numerical result changes

import numpy as np
import matplotlib.pyplot as plt
import matplotlib.animation as animation
from matplotlib.patches import FancyBboxPatch, Rectangle, FancyArrowPatch
from matplotlib.patheffects import withStroke
import networkx as nx

plt.rcParams["animation.embed_limit"] = 50

# ─── Extract existing results ───────────────────────────────────────────
anm = model.anm_
cce = result.cce
cai = result.cai

x_obs = np.asarray(cce.x_obs, dtype=float)
x_star = np.asarray(cce.x_star, dtype=float)
u_obs = np.asarray(cce.u_obs, dtype=float)
u_star = np.asarray(cce.u_star, dtype=float)

p = len(x_obs)
y_fact = float(cce.y_fact)
y_achieved = float(cce.y_achieved)
target_prob = 0.55

# Feature names
if hasattr(result, "feature_names") and result.feature_names is not None:
    feature_names = list(result.feature_names)
else:
    feature_names = [f"X{i+1}" for i in range(p)]

# ─── Figure setup ───────────────────────────────────────────────────────
fig = plt.figure(figsize=(12, 7))
fig.patch.set_facecolor("white")

gs = fig.add_gridspec(1, 2, width_ratios=[0.95, 1.85], hspace=0.3, wspace=0.30)

ax_left = fig.add_subplot(gs[0, 0])
ax_right = fig.add_subplot(gs[0, 1])

# ─── LEFT PANEL: Fixed pipeline with highlighting ──────────────────────
ax_left.set_xlim(0, 1)
ax_left.set_ylim(0, 1)
ax_left.axis("off")

# Header
ax_left.text(0.5, 0.97, "CAUSE", ha="center", va="top", 
            fontsize=24, fontweight="bold", color="darkblue")
ax_left.text(0.5, 0.91, "Causal Attribution\nUnified Structural\nExplanation", 
            ha="center", va="top", fontsize=7, style="italic", color="gray")

# Pipeline steps
steps = [
    ("1. Input x", 0),
    ("2. Learned\nDAG", 1),
    ("3. ANM/SCM", 2),
    ("4. x → u\n(inverse)", 3),
    ("5. Noise-space\nsearch", 4),
    ("6. u* → Φ(u*)\n(forward)", 5),
    ("7. x* compare", 6),
    ("8. Prediction\nflip", 7),
    ("9. CAI\nattribution", 8)
]

step_boxes = []
step_y_positions = {}

for i, (text, step_idx) in enumerate(steps):
    y = 0.85 - i * 0.092
    step_y_positions[step_idx] = y
    
    # Main box
    box = FancyBboxPatch(
        (0.08, y - 0.038),
        0.84,
        0.072,
        boxstyle="round,pad=0.008",
        linewidth=2,
        edgecolor="darkgray",
        facecolor="white"
    )
    ax_left.add_patch(box)
    
    txt = ax_left.text(
        0.5, y,
        text,
        ha="center", va="center",
        fontsize=9,
        fontweight="normal",
        color="black"
    )
    
    step_boxes.append((box, txt, step_idx))

# ─── RIGHT PANEL: Main animation area ───────────────────────────────────

# Helper: smooth interpolation with easing
def easeInOutCubic(t):
    """Smooth easing function."""
    t = np.clip(t, 0, 1)
    if t < 0.5:
        return 4 * t * t * t
    else:
        return 1 - ((-2 * t + 2) ** 3) / 2

# Helper: fade in alpha
def fade_in(t, duration=0.3):
    """Return alpha value for fade-in effect."""
    return np.clip(t / duration, 0, 1)

# Helper: get top changed features
def get_top_changed_features(n=8):
    deltas = np.abs(x_star - x_obs)
    top_idx = np.argsort(deltas)[::-1][:n]
    return top_idx

top_changed = get_top_changed_features(8)

# Helper: get top CAI features
cai_vals = np.asarray(cai.cai, dtype=float)
top_cai_idx = int(np.argmax(np.abs(cai_vals)))
top_cai_order = np.argsort(np.abs(cai_vals))[::-1][:9]

# Helper: get focused DAG
def get_focused_dag(G_full, focus_idx, radius=1):
    nodes = {focus_idx}
    for _ in range(radius):
        new_nodes = set()
        for n in nodes:
            new_nodes.update(G_full.predecessors(n))
            new_nodes.update(G_full.successors(n))
        nodes.update(new_nodes)
    
    nodes = list(nodes)[:22]
    G_sub = G_full.subgraph(nodes).copy()
    
    try:
        gens = list(nx.topological_generations(G_sub))
        pos = {}
        for level, gen in enumerate(gens):
            gen = list(gen)
            for k, node in enumerate(gen):
                if len(gen) == 1:
                    x_pos = 0.5
                else:
                    x_pos = 0.12 + 0.76 * k / (len(gen) - 1)
                y_pos = 0.82 - 0.68 * level / max(len(gens) - 1, 1)
                pos[node] = (x_pos, y_pos)
    except Exception:
        pos = nx.spring_layout(G_sub, seed=42, k=1.5, iterations=20)
    
    return G_sub, pos

# ─── Animation timing (FIXED: 5 FPS, recalculated boundaries) ──────────────
# ─── Animation timing — compact review version ───────────────────────

fps = 4.0
interval_ms = int(1000 / fps)

# ~30–35 second total animation

PHASE_1_INPUT = (0, 10)          # 2.5 sec
PHASE_1_5_TRANS = (10, 11)       # 0.25 sec

PHASE_2_DAG = (11, 27)           # 4 sec
PHASE_2_5_TRANS = (27, 28)       # 0.25 sec

PHASE_3_ANM = (28, 40)           # 3 sec
PHASE_3_5_TRANS = (40, 41)       # 0.25 sec

PHASE_4_INVERSE = (41, 53)       # 3 sec
PHASE_4_5_TRANS = (53, 54)       # 0.25 sec

PHASE_5_SEARCH = (54, 78)        # 6 sec
PHASE_5_5_TRANS = (78, 79)       # 0.25 sec

PHASE_6_FORWARD = (79, 91)       # 3 sec
PHASE_6_5_TRANS = (91, 92)       # 0.25 sec

PHASE_7_COMPARE = (92, 104)      # 3 sec
PHASE_7_5_TRANS = (104, 105)     # 0.25 sec

PHASE_8_PRED = (105, 117)        # 3 sec
PHASE_8_5_TRANS = (117, 118)     # 0.25 sec

PHASE_9_CAI = (118, 138)         # 5 sec
PHASE_9_HOLD = (138, 146)        # 2 sec

TOTAL_FRAMES = 146

# ─── Update function ───────────────────────────────────────────────────
def update(frame):
    ax_right.clear()
    ax_right.set_xlim(0, 1)
    ax_right.set_ylim(0, 1)
    ax_right.axis("off")
    
    # Reset all boxes to default state
    for box, txt, step_idx in step_boxes:
        box.set_facecolor("white")
        box.set_linewidth(2)
        box.set_edgecolor("darkgray")
        txt.set_fontweight("normal")
        txt.set_color("black")
    
    # ────────────────────────────────────────────────────────────────────
    # PHASE 1: INPUT — "What are we explaining?" — 5 seconds
    # ────────────────────────────────────────────────────────────────────
    if PHASE_1_INPUT[0] <= frame < PHASE_1_INPUT[1]:
        # Highlight
        for box, txt, idx in step_boxes:
            if idx == 0:
                box.set_facecolor("#ADD8E6")
                box.set_linewidth(3)
                box.set_edgecolor("darkblue")
                txt.set_fontweight("bold")
                txt.set_color("darkblue")
        
        alpha = fade_in(frame - PHASE_1_INPUT[0], 10)
        
        ax_right.text(0.5, 0.93, "Step 1 — Observed Instance", 
                     ha="center", fontsize=14, fontweight="bold", alpha=alpha)
        
        ax_right.text(0.5, 0.82, "Factual Prediction", 
                     ha="center", fontsize=11, fontweight="bold", alpha=alpha)
        
        # Prediction box
        pred_box = FancyBboxPatch((0.25, 0.74), 0.5, 0.06,
                                 boxstyle="round,pad=0.01",
                                 linewidth=2, edgecolor="darkgreen",
                                 facecolor="lightgreen", alpha=0.7*alpha)
        ax_right.add_patch(pred_box)
        
        ax_right.text(0.5, 0.77, f"E[f(x)] = {y_fact:.4f}",
                     ha="center", fontsize=13, fontweight="bold", color="darkgreen", alpha=alpha)
        
        # Feature list
        ax_right.text(0.05, 0.66, "Selected Features:", fontsize=10, fontweight="bold", alpha=alpha)
        for row, j in enumerate(top_changed[:6]):
            ax_right.text(0.08, 0.60 - row*0.08,
                         f"{feature_names[j]:<20} {x_obs[j]:>+.3f}",
                         fontsize=8, family="monospace", alpha=alpha)
        
        ax_right.text(0.5, 0.08, "Ready to explain this instance causally",
                     ha="center", fontsize=9, style="italic", alpha=alpha)
    
    # ────────────────────────────────────────────────────────────────────
    # TRANSITION 1→2: TRANSITION MESSAGE — 0.4 seconds
    # ────────────────────────────────────────────────────────────────────
    elif PHASE_1_5_TRANS[0] <= frame < PHASE_1_5_TRANS[1]:
        alpha = fade_in(frame - PHASE_1_5_TRANS[0], 2)
        
        ax_right.text(0.5, 0.6, "We now identify the causal structure",
                     ha="center", fontsize=13, fontweight="bold", 
                     color="darkblue", alpha=alpha)
        
        ax_right.text(0.5, 0.45, "Step 2: Learn the Causal DAG",
                     ha="center", fontsize=12, style="italic", 
                     color="gray", alpha=alpha)
    
    # ────────────────────────────────────────────────────────────────────
    # PHASE 2: DAG — "What causes what?" — 7 seconds
    # ────────────────────────────────────────────────────────────────────
    elif PHASE_2_DAG[0] <= frame < PHASE_2_DAG[1]:
        for box, txt, idx in step_boxes:
            if idx == 1:
                box.set_facecolor("#ADD8E6")
                box.set_linewidth(3)
                box.set_edgecolor("darkblue")
                txt.set_fontweight("bold")
                txt.set_color("darkblue")
        
        alpha = fade_in(frame - PHASE_2_DAG[0], 10)
        
        ax_right.text(0.5, 0.96, "Step 2 — Learned Causal DAG", 
                     ha="center", fontsize=14, fontweight="bold", alpha=alpha)
        
        ax_right.text(0.5, 0.90, "WHO influences WHOM?",
                     ha="center", fontsize=10, style="italic", 
                     color="darkgreen", alpha=alpha)
        
        # Build focused DAG
        G_sub, pos = get_focused_dag(G, top_cai_idx, radius=1)
        
        # Draw edges
        if alpha > 0.3:
            nx.draw_networkx_edges(G_sub, pos, ax=ax_right, arrows=True,
                                  arrowsize=10, width=1.2, edge_color="gray",
                                  connectionstyle="arc3,rad=0.05", alpha=alpha*0.8)
        
        # Draw nodes
        normal = [n for n in G_sub.nodes if n != top_cai_idx]
        
        if alpha > 0.2:
            nx.draw_networkx_nodes(G_sub, pos, nodelist=normal, ax=ax_right,
                                  node_size=500, node_color="white",
                                  edgecolors="gray", linewidths=1, alpha=alpha)
            
            # Highlight top CAI feature
            nx.draw_networkx_nodes(G_sub, pos, nodelist=[top_cai_idx], ax=ax_right,
                                  node_size=900, node_color="lightyellow",
                                  edgecolors="darkgoldenrod", linewidths=2.5, alpha=alpha)
        
        # Labels
        labels = {n: (feature_names[n] if n == top_cai_idx else f"X{n+1}")
                 for n in G_sub.nodes}
        nx.draw_networkx_labels(
                G_sub,
                pos,
                labels,
                ax=ax_right,
                font_size=7,
                alpha=alpha,
                font_weight="bold"
            )
        
        # Stats box
        stats_box = FancyBboxPatch((0.02, 0.02), 0.35, 0.12,
                                  boxstyle="round,pad=0.008",
                                  linewidth=1.5, edgecolor="darkgray",
                                  facecolor="lightyellow", alpha=0.6*alpha)
        ax_right.add_patch(stats_box)
        
        ax_right.text(0.04, 0.11, f"{p} features", fontsize=8, fontweight="bold", alpha=alpha)
        ax_right.text(0.04, 0.07, f"{G.number_of_edges()} learned edges", fontsize=8, alpha=alpha)
        ax_right.text(0.04, 0.03, "DAG: ✓ Acyclic", fontsize=8, alpha=alpha)
    
    # ────────────────────────────────────────────────────────────────────
    # TRANSITION 2→3: CONCEPTUAL BRIDGE — 0.4 seconds
    # ────────────────────────────────────────────────────────────────────
    elif PHASE_2_5_TRANS[0] <= frame < PHASE_2_5_TRANS[1]:
        alpha = fade_in(frame - PHASE_2_5_TRANS[0], 2)
        
        ax_right.text(0.5, 0.65, "DAG tells us WHO influences WHOM",
                     ha="center", fontsize=11, fontweight="bold", 
                     color="darkblue", alpha=alpha)
        
        ax_right.text(0.5, 0.50, "ANM/SCM tells us HOW they are related",
                     ha="center", fontsize=11, fontweight="bold", 
                     color="darkgreen", alpha=alpha)
        
        ax_right.text(0.5, 0.32, "Step 3: Structural Equation Model",
                     ha="center", fontsize=12, style="italic", 
                     color="gray", alpha=alpha)
    
    # ────────────────────────────────────────────────────────────────────
    # PHASE 3: ANM/SCM — "How are variables generated?" — 6 seconds
    # ────────────────────────────────────────────────────────────────────
    elif PHASE_3_ANM[0] <= frame < PHASE_3_ANM[1]:
        for box, txt, idx in step_boxes:
            if idx == 2:
                box.set_facecolor("#ADD8E6")
                box.set_linewidth(3)
                box.set_edgecolor("darkblue")
                txt.set_fontweight("bold")
                txt.set_color("darkblue")
        
        alpha = fade_in(frame - PHASE_3_ANM[0], 10)
        
        ax_right.text(0.5, 0.92, "Step 3 — Additive Noise Model", 
                     ha="center", fontsize=14, fontweight="bold", alpha=alpha)
        
        # Equation box
        eq_box = FancyBboxPatch((0.1, 0.68), 0.8, 0.15,
                               boxstyle="round,pad=0.01",
                               linewidth=2, edgecolor="darkblue",
                               facecolor="aliceblue", alpha=0.5*alpha)
        ax_right.add_patch(eq_box)
        
        ax_right.text(0.5, 0.80, "Structural Equation", 
                     ha="center", fontsize=11, fontweight="bold", alpha=alpha)
        ax_right.text(0.5, 0.72, r"$X_j = g_j(\text{Pa}(X_j)) + U_j$", 
                     ha="center", fontsize=16, alpha=alpha)
        
        # Key points
        ax_right.text(0.5, 0.58, "Each feature is generated by:", fontsize=10, 
                     fontweight="bold", alpha=alpha)
        
        pt1_box = Rectangle((0.08, 0.48), 0.38, 0.08, linewidth=1, 
                           edgecolor="gray", facecolor="white", alpha=0.6*alpha)
        ax_right.add_patch(pt1_box)
        ax_right.text(0.27, 0.52, "① Deterministic function\nof parent features", 
                     ha="center", fontsize=8, alpha=alpha)
        
        pt2_box = Rectangle((0.54, 0.48), 0.38, 0.08, linewidth=1, 
                           edgecolor="gray", facecolor="white", alpha=0.6*alpha)
        ax_right.add_patch(pt2_box)
        ax_right.text(0.73, 0.52, "② Plus independent\nnoise U", 
                     ha="center", fontsize=8, alpha=alpha)
        
        # Key insight
        insight_box = FancyBboxPatch((0.08, 0.18), 0.84, 0.10,
                                    boxstyle="round,pad=0.008",
                                    linewidth=2, edgecolor="darkred",
                                    facecolor="mistyrose", alpha=0.7*alpha)
        ax_right.add_patch(insight_box)
        
        ax_right.text(0.5, 0.25, "Key: Any noise u guarantees Φ(u) ∈ X_M", 
                     ha="center", fontsize=10, fontweight="bold", color="darkred", alpha=alpha)
        ax_right.text(0.5, 0.20, "This is the core of the manifold constraint ✓", 
                     ha="center", fontsize=9, style="italic", color="darkred", alpha=alpha)
    
    # ────────────────────────────────────────────────────────────────────
    # TRANSITION 3→4: WHY INVERSE TRANSFORM — 0.4 seconds
    # ────────────────────────────────────────────────────────────────────
    elif PHASE_3_5_TRANS[0] <= frame < PHASE_3_5_TRANS[1]:
        alpha = fade_in(frame - PHASE_3_5_TRANS[0], 2)
        
        ax_right.text(0.5, 0.60, "We can now recover the underlying noise",
                     ha="center", fontsize=11, fontweight="bold", 
                     color="darkblue", alpha=alpha)
        
        ax_right.text(0.5, 0.42, "Step 4: Transform from x-space to u-space",
                     ha="center", fontsize=12, style="italic", 
                     color="gray", alpha=alpha)
    
    # ────────────────────────────────────────────────────────────────────
    # PHASE 4: x → u (INVERSE) — "Extract underlying noise" — 6 seconds
    # ────────────────────────────────────────────────────────────────────
    elif PHASE_4_INVERSE[0] <= frame < PHASE_4_INVERSE[1]:
        for box, txt, idx in step_boxes:
            if idx == 3:
                box.set_facecolor("#ADD8E6")
                box.set_linewidth(3)
                box.set_edgecolor("darkblue")
                txt.set_fontweight("bold")
                txt.set_color("darkblue")
        
        alpha = fade_in(frame - PHASE_4_INVERSE[0], 10)
        
        ax_right.text(0.5, 0.92, "Step 4 — Transform to Noise Space", 
                     ha="center", fontsize=14, fontweight="bold", alpha=alpha)
        
        ax_right.text(0.5, 0.84, "Φ⁻¹: Extract the noise characterizing x",
                     ha="center", fontsize=10, style="italic", color="darkgreen", alpha=alpha)
        
        # Visual flow
        ax_right.text(0.5, 0.72, "Observed Instance", fontsize=11, 
                     fontweight="bold", alpha=alpha)
        
        obs_box = FancyBboxPatch((0.25, 0.65), 0.5, 0.05,
                                boxstyle="round,pad=0.005",
                                linewidth=2, edgecolor="darkgreen",
                                facecolor="lightgreen", alpha=0.7*alpha)
        ax_right.add_patch(obs_box)
        ax_right.text(0.5, 0.675, "x", ha="center", fontsize=16, 
                     fontweight="bold", color="darkgreen", alpha=alpha)
        
        # Arrow
        arrow = FancyArrowPatch((0.5, 0.62), (0.5, 0.50),
                              arrowstyle="-|>", mutation_scale=25, 
                              linewidth=2.5, color="darkblue", alpha=0.8*alpha)
        ax_right.add_patch(arrow)
        ax_right.text(0.58, 0.56, "Φ⁻¹", fontsize=11, fontweight="bold", alpha=alpha)
        
        # Noise space
        ax_right.text(0.5, 0.47, "Noise Space", fontsize=11, 
                     fontweight="bold", alpha=alpha)
        
        noise_box = FancyBboxPatch((0.25, 0.40), 0.5, 0.05,
                                  boxstyle="round,pad=0.005",
                                  linewidth=2, edgecolor="darkblue",
                                  facecolor="lightblue", alpha=0.7*alpha)
        ax_right.add_patch(noise_box)
        ax_right.text(0.5, 0.425, "u", ha="center", fontsize=16, 
                     fontweight="bold", color="darkblue", alpha=alpha)
        
        # Noise values
        ax_right.text(0.05, 0.30, "Noise Components:", fontsize=10, 
                     fontweight="bold", alpha=alpha)
        for i in range(min(5, len(u_obs))):
            ax_right.text(0.08, 0.24 - i*0.065,
                         f"u{i+1} = {u_obs[i]:>+7.4f}",
                         fontsize=8, family="monospace", alpha=alpha)
    
    # ────────────────────────────────────────────────────────────────────
    # TRANSITION 4→5: SEARCH MOTIVATION — 0.4 seconds
    # ────────────────────────────────────────────────────────────────────
    elif PHASE_4_5_TRANS[0] <= frame < PHASE_4_5_TRANS[1]:
        alpha = fade_in(frame - PHASE_4_5_TRANS[0], 2)
        
        ax_right.text(0.5, 0.60, "Now we search in noise space for a better state",
                     ha="center", fontsize=11, fontweight="bold", 
                     color="darkblue", alpha=alpha)
        
        ax_right.text(0.5, 0.42, "Step 5: Optimization begins",
                     ha="center", fontsize=12, style="italic", 
                     color="gray", alpha=alpha)
    
    # ────────────────────────────────────────────────────────────────────
    # PHASE 5: NOISE-SPACE SEARCH — "Find valid alternative" — 10 seconds
    # ────────────────────────────────────────────────────────────────────
    elif PHASE_5_SEARCH[0] <= frame < PHASE_5_SEARCH[1]:
        for box, txt, idx in step_boxes:
            if idx == 4:
                box.set_facecolor("#ADD8E6")
                box.set_linewidth(3)
                box.set_edgecolor("darkblue")
                txt.set_fontweight("bold")
                txt.set_color("darkblue")
        
        local_frame = frame - PHASE_5_SEARCH[0]
        local_duration = PHASE_5_SEARCH[1] - PHASE_5_SEARCH[0]
        progress = local_frame / local_duration
        progress = np.clip(progress, 0, 1)
        
        # Smooth interpolation
        t_smooth = easeInOutCubic(progress)
        
        alpha = fade_in(local_frame, 10)
        
        ax_right.text(0.5, 0.92, "Step 5 — Noise-Space Search", 
                     ha="center", fontsize=14, fontweight="bold", alpha=alpha)
        
        ax_right.text(0.5, 0.86, "Minimize causal distance subject to target prediction",
                     ha="center", fontsize=9, style="italic", color="darkgreen", alpha=alpha)
        
        # Progress bar
        ax_right.text(0.5, 0.78, f"Progress: {progress*100:.0f}%", 
                     ha="center", fontsize=11, fontweight="bold", alpha=alpha)
        
        progress_bar = Rectangle((0.1, 0.74), 0.8 * progress, 0.03,
                                linewidth=1, edgecolor="darkblue",
                                facecolor="skyblue", alpha=0.7*alpha)
        ax_right.add_patch(progress_bar)
        
        progress_outline = Rectangle((0.1, 0.74), 0.8, 0.03,
                                    linewidth=2, edgecolor="darkblue",
                                    facecolor="none", alpha=alpha)
        ax_right.add_patch(progress_outline)
        
        # Interpolated noise point
        u_interp = u_obs + t_smooth * (u_star - u_obs)
        
        # Current state box
        state_box = FancyBboxPatch((0.05, 0.54), 0.9, 0.16,
                                  boxstyle="round,pad=0.008",
                                  linewidth=1.5, edgecolor="gray",
                                  facecolor="lightyellow", alpha=0.5*alpha)
        ax_right.add_patch(state_box)
        
        ax_right.text(0.5, 0.68, "Current Noise Point", fontsize=11, 
                     fontweight="bold", ha="center", alpha=alpha)
        
        for i in range(min(5, len(u_interp))):
            ax_right.text(0.1, 0.61 - i*0.06,
                         f"u{i+1}(t) = {u_interp[i]:>+7.4f}",
                         fontsize=7, family="monospace", alpha=alpha)
        
        # Objective
        ax_right.text(0.5, 0.35, "Goal: Target Prediction ≥ " + f"{target_prob:.2f}", 
                     ha="center", fontsize=10, fontweight="bold", alpha=alpha)
        
        # Status
        status_msg = "Searching..." if progress < 0.9 else "Optimal point found ✓"
        status_color = "darkblue" if progress < 0.9 else "darkgreen"
        ax_right.text(0.5, 0.12, status_msg, ha="center", fontsize=11, 
                     fontweight="bold", color=status_color, alpha=alpha)
    
    # ────────────────────────────────────────────────────────────────────
    # TRANSITION 5→6: HOLD & TRANSITION to FORWARD — 0.4 seconds
    # ────────────────────────────────────────────────────────────────────
    elif PHASE_5_5_TRANS[0] <= frame < PHASE_5_5_TRANS[1]:
        alpha = fade_in(frame - PHASE_5_5_TRANS[0], 2)
        
        ax_right.text(0.5, 0.65, "Optimal noise point u* found",
                     ha="center", fontsize=12, fontweight="bold", 
                     color="darkgreen", alpha=alpha)
        
        ax_right.text(0.5, 0.48, "u* → Now decode back to feature space",
                     ha="center", fontsize=11, fontweight="bold", 
                     color="darkblue", alpha=alpha)
        
        ax_right.text(0.5, 0.28, "Step 6: Generate counterfactual x*",
                     ha="center", fontsize=12, style="italic", 
                     color="gray", alpha=alpha)
    
    # ────────────────────────────────────────────────────────────────────
    # PHASE 6: u* → Φ(u*) (FORWARD) — "Generate alternative" — 6 seconds
    # ────────────────────────────────────────────────────────────────────
    elif PHASE_6_FORWARD[0] <= frame < PHASE_6_FORWARD[1]:
        for box, txt, idx in step_boxes:
            if idx == 5:
                box.set_facecolor("#ADD8E6")
                box.set_linewidth(3)
                box.set_edgecolor("darkblue")
                txt.set_fontweight("bold")
                txt.set_color("darkblue")
        
        alpha = fade_in(frame - PHASE_6_FORWARD[0], 10)
        
        ax_right.text(0.5, 0.92, "Step 6 — Decode to Feature Space", 
                     ha="center", fontsize=14, fontweight="bold", alpha=alpha)
        
        ax_right.text(0.5, 0.84, "Φ: Generate causally plausible features from u*",
                     ha="center", fontsize=10, style="italic", color="darkgreen", alpha=alpha)
        
        # Flow diagram
        ax_right.text(0.5, 0.72, "Optimal Noise Point", fontsize=11, 
                     fontweight="bold", alpha=alpha)
        
        noise_opt_box = FancyBboxPatch((0.25, 0.65), 0.5, 0.05,
                                      boxstyle="round,pad=0.005",
                                      linewidth=2, edgecolor="darkblue",
                                      facecolor="lightblue", alpha=0.7*alpha)
        ax_right.add_patch(noise_opt_box)
        ax_right.text(0.5, 0.675, "u*", ha="center", fontsize=16, 
                     fontweight="bold", color="darkblue", alpha=alpha)
        
        # Arrow
        arrow = FancyArrowPatch((0.5, 0.62), (0.5, 0.50),
                              arrowstyle="-|>", mutation_scale=25, 
                              linewidth=2.5, color="darkred", alpha=0.8*alpha)
        ax_right.add_patch(arrow)
        ax_right.text(0.58, 0.56, "Φ", fontsize=11, fontweight="bold", alpha=alpha)
        
        # Feature space
        ax_right.text(0.5, 0.47, "Counterfactual Instance", fontsize=11, 
                     fontweight="bold", alpha=alpha)
        
        cf_box = FancyBboxPatch((0.25, 0.40), 0.5, 0.05,
                               boxstyle="round,pad=0.005",
                               linewidth=2, edgecolor="darkred",
                               facecolor="mistyrose", alpha=0.7*alpha)
        ax_right.add_patch(cf_box)
        ax_right.text(0.5, 0.425, "x*", ha="center", fontsize=16, 
                     fontweight="bold", color="darkred", alpha=alpha)
        
        # Feature values
        ax_right.text(0.05, 0.30, "Counterfactual Features:", fontsize=10, 
                     fontweight="bold", alpha=alpha)
        for row, j in enumerate(top_changed[:4]):
            delta = x_star[j] - x_obs[j]
            ax_right.text(0.08, 0.24 - row*0.075,
                         f"{feature_names[j]:<20} {x_star[j]:>+.3f}  Δ {delta:>+.3f}",
                         fontsize=7, family="monospace", alpha=alpha)
    
    # ────────────────────────────────────────────────────────────────────
    # TRANSITION 6→7: COMPARISON SETUP — 0.4 seconds
    # ────────────────────────────────────────────────────────────────────
    elif PHASE_6_5_TRANS[0] <= frame < PHASE_6_5_TRANS[1]:
        alpha = fade_in(frame - PHASE_6_5_TRANS[0], 2)
        
        ax_right.text(0.5, 0.60, "Counterfactual x* has been generated",
                     ha="center", fontsize=11, fontweight="bold", 
                     color="darkgreen", alpha=alpha)
        
        ax_right.text(0.5, 0.42, "Step 7: Compare with the original",
                     ha="center", fontsize=12, style="italic", 
                     color="gray", alpha=alpha)
    
    # ────────────────────────────────────────────────────────────────────
    # PHASE 7: COMPARISON — "What changed?" — 7 seconds
    # ────────────────────────────────────────────────────────────────────
    elif PHASE_7_COMPARE[0] <= frame < PHASE_7_COMPARE[1]:
        for box, txt, idx in step_boxes:
            if idx == 6:
                box.set_facecolor("#ADD8E6")
                box.set_linewidth(3)
                box.set_edgecolor("darkblue")
                txt.set_fontweight("bold")
                txt.set_color("darkblue")
        
        alpha = fade_in(frame - PHASE_7_COMPARE[0], 10)
        
        ax_right.text(0.5, 0.94, "Step 7 — What Changed?", 
                     ha="center", fontsize=13, fontweight="bold", alpha=alpha)
        
        # Left column — original
        left_box = FancyBboxPatch((0.04, 0.50), 0.42, 0.40,
                                 boxstyle="round,pad=0.008",
                                 linewidth=2, edgecolor="darkgreen",
                                 facecolor="honeydew", alpha=0.5*alpha)
        ax_right.add_patch(left_box)
        
        ax_right.text(0.25, 0.87, "FACTUAL", fontsize=11, fontweight="bold",
                     ha="center", color="darkgreen", alpha=alpha)
        
        ax_right.text(0.07, 0.82, "Feature", fontsize=8, fontweight="bold", alpha=alpha)
        ax_right.text(0.28, 0.82, "Value", fontsize=8, fontweight="bold", alpha=alpha)
        
        for row, j in enumerate(top_changed[:8]):
            ax_right.text(0.07, 0.77 - row*0.035,
                         feature_names[j][:15], fontsize=7, alpha=alpha)
            ax_right.text(0.28, 0.77 - row*0.035,
                         f"{x_obs[j]:>+.2f}", fontsize=7, family="monospace",
                         color="darkgreen", alpha=alpha)
        
        # Center arrow
        arrow = FancyArrowPatch((0.48, 0.70), (0.52, 0.70),
                              arrowstyle="<->", mutation_scale=20, 
                              linewidth=2, color="black", alpha=0.6*alpha)
        ax_right.add_patch(arrow)
        
        # Right column — counterfactual
        right_box = FancyBboxPatch((0.54, 0.50), 0.42, 0.40,
                                  boxstyle="round,pad=0.008",
                                  linewidth=2, edgecolor="darkred",
                                  facecolor="mistyrose", alpha=0.5*alpha)
        ax_right.add_patch(right_box)
        
        ax_right.text(0.75, 0.87, "COUNTERFACTUAL", fontsize=11, fontweight="bold",
                     ha="center", color="darkred", alpha=alpha)
        
        ax_right.text(0.57, 0.82, "Feature", fontsize=8, fontweight="bold", alpha=alpha)
        ax_right.text(0.78, 0.82, "Value", fontsize=8, fontweight="bold", alpha=alpha)
        
        for row, j in enumerate(top_changed[:8]):
            ax_right.text(0.57, 0.77 - row*0.035,
                         feature_names[j][:15], fontsize=7, alpha=alpha)
            ax_right.text(0.78, 0.77 - row*0.035,
                         f"{x_star[j]:>+.2f}", fontsize=7, family="monospace",
                         color="darkred", alpha=alpha)
        
        # Summary
        ax_right.text(0.5, 0.10, f"{len([j for j in range(p) if abs(x_star[j]-x_obs[j])>0.05])} features changed",
                     ha="center", fontsize=9, style="italic", alpha=alpha)
    
    # ────────────────────────────────────────────────────────────────────
    # TRANSITION 7→8: PREDICTION CHECK SETUP — 0.4 seconds
    # ────────────────────────────────────────────────────────────────────
    elif PHASE_7_5_TRANS[0] <= frame < PHASE_7_5_TRANS[1]:
        alpha = fade_in(frame - PHASE_7_5_TRANS[0], 2)
        
        ax_right.text(0.5, 0.60, "Now we check if the prediction changed",
                     ha="center", fontsize=11, fontweight="bold", 
                     color="darkblue", alpha=alpha)
        
        ax_right.text(0.5, 0.42, "Step 8: Did we reach the target?",
                     ha="center", fontsize=12, style="italic", 
                     color="gray", alpha=alpha)
    
    # ────────────────────────────────────────────────────────────────────
    # PHASE 8: PREDICTION FLIP — "Did prediction change?" — 7 seconds
    # ────────────────────────────────────────────────────────────────────
    elif PHASE_8_PRED[0] <= frame < PHASE_8_PRED[1]:
        for box, txt, idx in step_boxes:
            if idx == 7:
                box.set_facecolor("#ADD8E6")
                box.set_linewidth(3)
                box.set_edgecolor("darkblue")
                txt.set_fontweight("bold")
                txt.set_color("darkblue")
        
        local_frame = frame - PHASE_8_PRED[0]
        local_duration = PHASE_8_PRED[1] - PHASE_8_PRED[0]
        progress = local_frame / local_duration
        progress = np.clip(progress, 0, 1)
        
        alpha = fade_in(local_frame, 10)
        
        ax_right.text(0.5, 0.94, "Step 8 — Did the Prediction Change?", 
                     ha="center", fontsize=14, fontweight="bold", alpha=alpha)
        
        # Stage 1: Factual
        ax_right.text(0.25, 0.82, "FACTUAL", fontsize=11, fontweight="bold",
                     ha="center", color="darkgreen", alpha=alpha)
        
        fact_box = FancyBboxPatch((0.08, 0.70), 0.34, 0.08,
                                 boxstyle="round,pad=0.008",
                                 linewidth=2, edgecolor="darkgreen",
                                 facecolor="lightgreen", alpha=0.7*alpha)
        ax_right.add_patch(fact_box)
        
        ax_right.text(0.25, 0.76, f"P(class=1) = {y_fact:.4f}", fontsize=12,
                     fontweight="bold", ha="center", color="darkgreen", alpha=alpha)
        
        # Stage 2: Arrow (appear after 30% progress)
        if progress > 0.20:
            arrow_alpha = fade_in(progress - 0.20, 0.3)
            arrow = FancyArrowPatch((0.44, 0.74), (0.56, 0.74),
                                  arrowstyle="-|>", mutation_scale=25, 
                                  linewidth=3, color="black", alpha=0.8*arrow_alpha)
            ax_right.add_patch(arrow)
        
        # Stage 3: Counterfactual (appear after 40% progress)
        if progress > 0.30:
            cf_alpha = fade_in(progress - 0.30, 0.3)
            
            ax_right.text(0.75, 0.82, "COUNTERFACTUAL", fontsize=11, fontweight="bold",
                         ha="center", color="darkred", alpha=cf_alpha)
            
            cf_box = FancyBboxPatch((0.58, 0.70), 0.34, 0.08,
                                   boxstyle="round,pad=0.008",
                                   linewidth=2, edgecolor="darkred",
                                   facecolor="mistyrose", alpha=0.7*cf_alpha)
            ax_right.add_patch(cf_box)
            
            ax_right.text(0.75, 0.76, f"P(class=1) = {y_achieved:.4f}", fontsize=12,
                         fontweight="bold", ha="center", color="darkred", alpha=cf_alpha)
        
        # Target boundary line
        target_y_px = 0.55 + (target_prob - 0.4) * 0.15 / 0.3
        ax_right.axhline(target_y_px, xmin=0.08/1.0, xmax=0.92/1.0,
                        linestyle="--", linewidth=2, color="orange", alpha=0.7*alpha)
        ax_right.text(0.02, target_y_px, f"Target={target_prob:.2f}", fontsize=8,
                     color="orange", fontweight="bold", alpha=alpha)
        
        # Success indicator (appear after 60% progress)
        if progress > 0.50:
            success_alpha = fade_in(progress - 0.50, 0.3)
            
            reached = y_achieved >= target_prob
            status_txt = "✓ TARGET REACHED" if reached else "✗ TARGET MISSED"
            status_color = "darkgreen" if reached else "darkred"
            
            status_box = FancyBboxPatch((0.15, 0.32), 0.70, 0.10,
                                       boxstyle="round,pad=0.01",
                                       linewidth=2.5, edgecolor=status_color,
                                       facecolor="white", alpha=0.8*success_alpha)
            ax_right.add_patch(status_box)
            
            ax_right.text(0.5, 0.41, status_txt, ha="center", fontsize=13,
                         fontweight="bold", color=status_color, alpha=success_alpha)
        
        # CVR check (hold at end)
        if progress > 0.70:
            cvr_alpha = fade_in(progress - 0.70, 0.25)
            vm = cce.violation
            cvr_ok = vm < 1.5
            cvr_txt = f"V_M = {vm:.3f}  ✓ on-manifold" if cvr_ok else f"V_M = {vm:.3f}  ⚠ off-manifold"
            cvr_color = "darkgreen" if cvr_ok else "orange"
            
            ax_right.text(0.5, 0.12, cvr_txt, ha="center", fontsize=10,
                         style="italic", color=cvr_color, alpha=cvr_alpha)
    
    # ────────────────────────────────────────────────────────────────────
    # TRANSITION 8→9: CONCEPTUAL BRIDGE TO CAI — 0.4 seconds
    # ────────────────────────────────────────────────────────────────────
    elif PHASE_8_5_TRANS[0] <= frame < PHASE_8_5_TRANS[1]:
        alpha = fade_in(frame - PHASE_8_5_TRANS[0], 2)
        
        ax_right.text(0.5, 0.68, "✓ CCE answers: HOW can we change the instance?",
                     ha="center", fontsize=11, fontweight="bold", 
                     color="darkblue", alpha=alpha)
        
        ax_right.text(0.5, 0.44, "CAI answers: WHICH features causally matter?",
                     ha="center", fontsize=11, fontweight="bold", 
                     color="darkgreen", alpha=alpha)
        
        ax_right.text(0.5, 0.20, "Step 9: Causal Attribution Index",
                     ha="center", fontsize=12, style="italic", 
                     color="gray", alpha=alpha)
    
    # ────────────────────────────────────────────────────────────────────
    # PHASE 9: CAI ATTRIBUTION — "Which features causally matter?" — 10 seconds
    # ────────────────────────────────────────────────────────────────────
    elif PHASE_9_CAI[0] <= frame < PHASE_9_CAI[1]:
        for box, txt, idx in step_boxes:
            if idx == 8:
                box.set_facecolor("#ADD8E6")
                box.set_linewidth(3)
                box.set_edgecolor("darkblue")
                txt.set_fontweight("bold")
                txt.set_color("darkblue")
        
        local_frame = frame - PHASE_9_CAI[0]
        local_duration = PHASE_9_CAI[1] - PHASE_9_CAI[0]
        progress = local_frame / local_duration
        progress = np.clip(progress, 0, 1)
        
        alpha = fade_in(local_frame, 15)
        
        # ────────────────────────────────────────────────────────────────
        # TITLE
        # ────────────────────────────────────────────────────────────────
        ax_right.text(0.5, 0.96, "Step 9 — Causal Attribution Index (CAI)", 
                     ha="center", fontsize=14, fontweight="bold", alpha=alpha)
        
        # ────────────────────────────────────────────────────────────────
        # BASELINE EXPLANATION
        # ────────────────────────────────────────────────────────────────
        baseline_stage_alpha = fade_in(progress * 5 - 0, 0.8)
        if baseline_stage_alpha > 0.01:
            
            baseline_box = FancyBboxPatch((0.1, 0.82), 0.8, 0.08,
                                         boxstyle="round,pad=0.008",
                                         linewidth=2, edgecolor="darkblue",
                                         facecolor="aliceblue", alpha=0.5*baseline_stage_alpha)
            ax_right.add_patch(baseline_box)
            
            ax_right.text(0.5, 0.87, "Baseline (no intervention):", fontsize=11, 
                         fontweight="bold", ha="center", alpha=baseline_stage_alpha)
            ax_right.text(0.5, 0.83, f"E_M[f(X)] = {cai.baseline:.4f}", fontsize=12, 
                         fontweight="bold", ha="center", color="darkblue", alpha=baseline_stage_alpha)
        
        # ────────────────────────────────────────────────────────────────
        # INTERVENTION EXPLANATION
        # ────────────────────────────────────────────────────────────────
        intervention_stage_alpha = fade_in(progress * 5 - 1.0, 0.8)
        if intervention_stage_alpha > 0.01:
            
            intervention_box = FancyBboxPatch((0.1, 0.68), 0.8, 0.10,
                                            boxstyle="round,pad=0.008",
                                            linewidth=2, edgecolor="darkgreen",
                                            facecolor="honeydew", alpha=0.5*intervention_stage_alpha)
            ax_right.add_patch(intervention_box)
            
            ax_right.text(0.5, 0.75, "Causal effect for each feature:", fontsize=11, 
                         fontweight="bold", ha="center", alpha=intervention_stage_alpha)
            ax_right.text(0.5, 0.71, "CAI(X_j) = E[f | do(X_j = x_j)] - E_M[f(X)]", fontsize=11, 
                         ha="center", style="italic", alpha=intervention_stage_alpha)
        
        # ────────────────────────────────────────────────────────────────
        # TOP CAI FEATURES — Progressive reveal
        # ────────────────────────────────────────────────────────────────
        features_stage_alpha = fade_in(progress * 5 - 2.0, 0.8)
        if features_stage_alpha > 0.01:
            
            ax_right.text(0.05, 0.63, "Top Causal Drivers:", fontsize=11, 
                         fontweight="bold", alpha=features_stage_alpha)
            
            # Sequential reveal of individual features
            n_features_to_show = int(
                (progress - 0.40) / 0.60
                * len(top_cai_order)
            )
            n_features_to_show = max(1, min(n_features_to_show, len(top_cai_order)))
            
            max_cai = max(np.abs(cai_vals)) + 1e-8
            
            for row, j in enumerate(top_cai_order[:n_features_to_show]):
                
                # Fade in for this specific feature
                feature_fade = fade_in(
                    (progress - 0.40) * len(top_cai_order) - row,
                    0.6
                )
                
                if feature_fade < 0.01:
                    continue
                
                y_pos = 0.58 - row * 0.065
                cai_val = cai_vals[j]
                
                # Feature name
                ax_right.text(
                    0.08, y_pos,
                    feature_names[j],
                    fontsize=9, fontweight="bold",
                    alpha=feature_fade
                )
                
                # CAI value bar
                bar_width = 0.18
                
                if cai_val >= 0:
                    bar_color = "#27ae60"
                    rect_x = 0.40
                    rect_w = bar_width * (cai_val / max_cai)
                else:
                    bar_color = "#e74c3c"
                    rect_x = 0.40 + bar_width * (cai_val / max_cai)
                    rect_w = -bar_width * (cai_val / max_cai)
                
                bar_rect = Rectangle(
                    (rect_x, y_pos - 0.012),
                    rect_w, 0.028,
                    linewidth=0, facecolor=bar_color,
                    alpha=0.75 * feature_fade
                )
                ax_right.add_patch(bar_rect)
                
                # CAI value (numeric)
                ax_right.text(
                    0.60, y_pos,
                    f"{cai_val:+.4f}",
                    fontsize=8, family="monospace",
                    fontweight="bold", alpha=feature_fade
                )
                
                # Standard Error (if available)
                if cai.standard_errors is not None:
                    se = cai.standard_errors[j]
                    ax_right.text(
                        0.72, y_pos + 0.008,
                        f"SE={se:.4f}",
                        fontsize=7, family="monospace",
                        alpha=0.7 * feature_fade
                    )
                    
                    # 95% Confidence Interval (if available)
                    if cai.confidence_intervals is not None:
                        ci_lower, ci_upper = cai.confidence_intervals[j]
                        ax_right.text(
                            0.72, y_pos - 0.010,
                            f"95% CI [{ci_lower:+.3f}, {ci_upper:+.3f}]",
                            fontsize=7, family="monospace",
                            alpha=0.6 * feature_fade
                        )
        
        # ────────────────────────────────────────────────────────────────
        # STRONGEST DRIVER HIGHLIGHT (final 25% of animation)
        # ────────────────────────────────────────────────────────────────
        if progress > 0.75:
            
            highlight_alpha = fade_in(progress - 0.75, 0.25)
            
            highlight_box = FancyBboxPatch(
                (0.05, 0.02), 0.9, 0.09,
                boxstyle="round,pad=0.01",
                linewidth=2.5, edgecolor="darkgoldenrod",
                facecolor="lightyellow",
                alpha=0.7 * highlight_alpha
            )
            ax_right.add_patch(highlight_box)
            
            top_feature = feature_names[top_cai_idx]
            top_value = cai_vals[top_cai_idx]
            
            if top_value > 0:
                trend = "causally INCREASES"
                icon = "↑"
                color = "darkgreen"
            else:
                trend = "causally DECREASES"
                icon = "↓"
                color = "darkred"
            
            ax_right.text(
                0.5, 0.085,
                f"⭐ Strongest driver: {icon} {top_feature}",
                ha="center", fontsize=12, fontweight="bold",
                color=color, alpha=highlight_alpha
            )
            
            ax_right.text(
                0.5, 0.035,
                f"{trend} prediction by {abs(top_value):.4f}",
                ha="center", fontsize=10,
                color=color, alpha=highlight_alpha
            )
    
    # ────────────────────────────────────────────────────────────────────
    # PHASE 9 HOLD — 5 seconds final hold (COMPLETE CAI DISPLAY)
    # ────────────────────────────────────────────────────────────────────
    else:  # PHASE_9_HOLD[0] <= frame < PHASE_9_HOLD[1]
        for box, txt, idx in step_boxes:
            if idx == 8:
                box.set_facecolor("#ADD8E6")
                box.set_linewidth(3)
                box.set_edgecolor("darkblue")
                txt.set_fontweight("bold")
                txt.set_color("darkblue")
        
        alpha = 1.0
        
        # ────────────────────────────────────────────────────────────────
        # TITLE
        # ────────────────────────────────────────────────────────────────
        ax_right.text(0.5, 0.96, "Step 9 — Causal Attribution Index (CAI)", 
                     ha="center", fontsize=14, fontweight="bold", alpha=alpha)
        
        # ────────────────────────────────────────────────────────────────
        # BASELINE
        # ────────────────────────────────────────────────────────────────
        baseline_box = FancyBboxPatch((0.1, 0.82), 0.8, 0.08,
                                     boxstyle="round,pad=0.008",
                                     linewidth=2, edgecolor="darkblue",
                                     facecolor="aliceblue", alpha=0.5)
        ax_right.add_patch(baseline_box)
        
        ax_right.text(0.5, 0.87, "Baseline (no intervention):", fontsize=11, 
                     fontweight="bold", ha="center", alpha=alpha)
        ax_right.text(0.5, 0.83, f"E_M[f(X)] = {cai.baseline:.4f}", fontsize=12, 
                     fontweight="bold", ha="center", color="darkblue", alpha=alpha)
        
        # ────────────────────────────────────────────────────────────────
        # FORMULA
        # ────────────────────────────────────────────────────────────────
        formula_box = FancyBboxPatch((0.1, 0.68), 0.8, 0.10,
                                    boxstyle="round,pad=0.008",
                                    linewidth=2, edgecolor="darkgreen",
                                    facecolor="honeydew", alpha=0.5)
        ax_right.add_patch(formula_box)
        
        ax_right.text(0.5, 0.75, "Causal effect for each feature:", fontsize=11, 
                     fontweight="bold", ha="center", alpha=alpha)
        ax_right.text(0.5, 0.71, "CAI(X_j) = E[f | do(X_j = x_j)] - E_M[f(X)]", fontsize=11, 
                     ha="center", style="italic", alpha=alpha)
        
        # ────────────────────────────────────────────────────────────────
        # TOP CAI FEATURES — ALL VISIBLE
        # ────────────────────────────────────────────────────────────────
        ax_right.text(0.05, 0.63, "Top Causal Drivers:", fontsize=11, 
                     fontweight="bold", alpha=alpha)
        
        max_cai = max(np.abs(cai_vals)) + 1e-8
        
        for row, j in enumerate(top_cai_order[:min(8, len(top_cai_order))]):
            
            y_pos = 0.58 - row * 0.065
            cai_val = cai_vals[j]
            
            # Feature name
            ax_right.text(
                0.08, y_pos,
                feature_names[j],
                fontsize=9, fontweight="bold",
                alpha=alpha
            )
            
            # CAI bar
            bar_width = 0.18
            
            if cai_val >= 0:
                bar_color = "#27ae60"
                rect_x = 0.40
                rect_w = bar_width * (cai_val / max_cai)
            else:
                bar_color = "#e74c3c"
                rect_x = 0.40 + bar_width * (cai_val / max_cai)
                rect_w = -bar_width * (cai_val / max_cai)
            
            bar_rect = Rectangle(
                (rect_x, y_pos - 0.012),
                rect_w, 0.028,
                linewidth=0, facecolor=bar_color,
                alpha=0.75
            )
            ax_right.add_patch(bar_rect)
            
            # CAI value
            ax_right.text(
                0.60, y_pos,
                f"{cai_val:+.4f}",
                fontsize=8, family="monospace",
                fontweight="bold", alpha=alpha
            )
            
            # SE and CI
            if cai.standard_errors is not None:
                
                se = cai.standard_errors[j]
                
                ax_right.text(
                    0.72, y_pos + 0.008,
                    f"SE={se:.4f}",
                    fontsize=7, family="monospace",
                    alpha=0.7
                )
                
                if cai.confidence_intervals is not None:
                    ci_lower, ci_upper = cai.confidence_intervals[j]
                    
                    ax_right.text(
                        0.72, y_pos - 0.010,
                        f"95% CI [{ci_lower:+.3f}, {ci_upper:+.3f}]",
                        fontsize=7, family="monospace",
                        alpha=0.6
                    )
        
        # ────────────────────────────────────────────────────────────────
        # STRONGEST DRIVER HIGHLIGHT
        # ────────────────────────────────────────────────────────────────
        highlight_box = FancyBboxPatch(
            (0.05, 0.02), 0.9, 0.09,
            boxstyle="round,pad=0.01",
            linewidth=2.5, edgecolor="darkgoldenrod",
            facecolor="lightyellow", alpha=0.7
        )
        ax_right.add_patch(highlight_box)
        
        top_feature = feature_names[top_cai_idx]
        top_value = cai_vals[top_cai_idx]
        
        if top_value > 0:
            trend = "causally INCREASES"
            icon = "↑"
            color = "darkgreen"
        else:
            trend = "causally DECREASES"
            icon = "↓"
            color = "darkred"
        
        ax_right.text(
            0.5, 0.085,
            f"⭐ Strongest driver: {icon} {top_feature}",
            ha="center", fontsize=12, fontweight="bold",
            color=color, alpha=alpha
        )
        
        ax_right.text(
            0.5, 0.035,
            f"{trend} prediction by {abs(top_value):.4f}",
            ha="center", fontsize=10,
            color=color, alpha=alpha
        )

    return []

# ─── Create animation ──────────────────────────────────────────────────
anim = animation.FuncAnimation(
    fig, update,
    frames=TOTAL_FRAMES,
    interval=interval_ms,
    blit=False,
    repeat=True
)

plt.tight_layout()
plt.close(fig)

# ─── Diagnostic print ──────────────────────────────────────────────────
print(
    "Animation:",
    TOTAL_FRAMES,
    "frames |",
    TOTAL_FRAMES / fps,
    "seconds |",
    "CAI starts at frame",
    PHASE_9_CAI[0],
    "| CAI ends at frame",
    PHASE_9_HOLD[1],
    "✓"
)

# ─── Display with explicit FPS ────────────────────────────────────────
display(HTML(anim.to_jshtml(fps=4)))

print("✅ Improved animation created successfully")
print("✅ Smooth transitions between all 9 steps")
print("✅ Clear narrative: CCE (what) → CAI (why)")
print("✅ Step 9 CAI attribution FULLY VISIBLE and holds for 5 seconds")

Animation: 146 frames | 36.5 seconds | CAI starts at frame 118 | CAI ends at frame 146 ✓


✅ Improved animation created successfully
✅ Smooth transitions between all 9 steps
✅ Clear narrative: CCE (what) → CAI (why)
✅ Step 9 CAI attribution FULLY VISIBLE and holds for 5 seconds
